# <font color="red">**Higher-Dimensional Optical Data Visualization Challenge**</font>

## Composition → spectrum → measurement context

### The problem

Optical libraries are difficult to visualize because every sample has a composition,
a full spectrum, a measurement geometry, and sometimes an elapsed-time history. A
collection of separate plots makes comparisons slow, but forcing everything into one
crowded plot can hide the spectral evidence.

> **Can we make all of those variables easier to explore without hiding the spectra
> or compressing the experiment into a single unexplained score?**

### The approach

Like the example EELS hackathon notebook, this notebook follows one linear pattern:

1. inspect the data and its dimensions;
2. run one complete, deliberately simple worked example;
3. modify that baseline in a clearly marked challenge cell;
4. test whether a new user can answer the stated scientific question.

### Choose one challenge

1. **Challenge 1 — Quaternary System:** connect FA/Cs/Rb/DMA composition and I/Br variation to
   Top PL, Bottom PL, and absorbance.
2. **Challenge 2 — RP-Additive System:** connect 3AMP/FAPbI3 host composition and nominal MACl
   level to Top/Bottom PL over 0–380 minutes.

### Your final result

- one visualization that answers a specific scientific question;
- the full spectral evidence remains reachable or visible;
- one sentence explaining what became easier to see and one possible misinterpretation.

The worked examples are deliberately simple baselines not
the expected final answer.


[![Open In Colab](https://colab.research.google.com/assets/colab-badge.svg)](https://colab.research.google.com/)

### How to run this notebook in Google Colab

1. Open it in Colab (*File → Upload notebook*, or open the shared Drive link with **Google Colaboratory**).
2. Click **Runtime → Run all**. The whole notebook takes about a minute on a free CPU runtime.
3. **No downloads or Drive access needed** — both challenge datasets are bundled *inside* this notebook
   (step 2 unpacks and checksum-verifies them into `/content/higher_dimensional_optical_data`).
4. The figures are interactive (hover, zoom, the time slider and the well dropdown all work in Colab).
5. Step 6 at the end writes both solutions as standalone HTML files; tick `DOWNLOAD_HTML` there if you want
   them downloaded to your computer.

*Prepared by Surya for the CAMM / Athena hackathon (Day 19 — higher-dimensional optical data).*

## <font color="green">My solution — Surya</font>

I worked through **both** challenges in this notebook. Everything above the challenge cells is the original
starter code (I only changed the data cells so the datasets are bundled inside this notebook). My own work starts at the
cells marked *"My Challenge 1 …"* and *"My Challenge 2 …"*, and my written answers are in the green
**"My answer"** sections right after each challenge cell.

What I did, in short:

1. I ran the baseline first and looked at a lot of raw spectra before designing anything.
2. That showed me two signal problems that the provided summaries hide (edge spikes / blue-end background in
   Challenge 1, and a blue-end tail that looks like "410 nm emission" in Challenge 2), so I built slightly more
   robust spectral features first.
3. Then I designed views that keep **every spectrum visible** (a "spectral glyph" plate map for Challenge 1 and a
   whole-plate time × wavelength mosaic for Challenge 2), with summary plots and evidence spectra next to them.
4. I exported both solutions as standalone interactive HTML files at the end.


<h2><font color="purple">1.</font> Set Up and Load the Data</h2>

Run the next cells from top to bottom. The two challenge datasets (≈ 2.7 MB in total) are embedded in this
notebook as a compressed bundle, so this works for anyone with the link — no Google Drive permissions and no
external downloads. The unpack cell is safe to rerun: it reuses an already-verified copy.

In [ ]:
# @title 1. Install (only if missing) and import the small analysis stack
# Colab already ships pandas, numpy, pyarrow and plotly, so normally nothing is installed here.
import importlib.util, subprocess, sys

_needed = {"pyarrow": "pyarrow>=14", "plotly": "plotly>=5.22"}
_missing = [spec for module, spec in _needed.items() if importlib.util.find_spec(module) is None]
if _missing:
    subprocess.run([sys.executable, "-m", "pip", "install", "-q", *_missing], check=True)

from html import escape
from pathlib import Path
import base64
import hashlib
import io
import os
import shutil
import zipfile

import numpy as np
import pandas as pd
import plotly.express as px
import plotly.graph_objects as go
import plotly.io as pio
from plotly.subplots import make_subplots
from IPython.display import FileLink, HTML, Markdown, display

IN_COLAB = "google.colab" in sys.modules
print("Running in Colab:", IN_COLAB, "| plotly", __import__("plotly").__version__,
      "| pandas", pd.__version__)

Running in Colab: True | plotly 5.24.1 | pandas 2.2.3


In [ ]:
# @title 2a. Bundled datasets (compressed + base64; hidden — no need to open this cell)
DATA_BUNDLE_SHA256 = {'01_hochan_quaternary_data/README_DATA.md': '0017114e85a4441f783a927a9784d2984ea34fbcb06a949cccd204f891cb6e62', '01_hochan_quaternary_data/composition_and_recipe.csv': '515e6c534af541fc4d4ebbe15f538aa21d4f3a6931df2deef037b6ccb8e4ef8d', '01_hochan_quaternary_data/measurement_manifest.csv': '5bf3cbcd4d46f617400a12a3bfbe43a96e101165be2464c530433bf17b561917', '01_hochan_quaternary_data/optical_read_qc_summary.csv': '8380153b452396534b6528a641eb8c841d33419d004a5b05bb4e9d210054e4be', '01_hochan_quaternary_data/optical_spectra_long.parquet': '7cdd814e5c9c2cf043007df9199fd46bb2dd529d66bcb7546a742b44acbe4eba', '02_rp_additive_data/README_DATA.md': '2524561584f56dfcdfa440d1ec5bca89f0b17472688ca0ecbced25d466adef9c', '02_rp_additive_data/composition_and_recipe.csv': 'e3cc0d18b4adde9266b4f6a9eb2b332639c07a910800e280a33d8ea48951b1f2', '02_rp_additive_data/metadata_features.parquet': 'ae267beb7cd8cbb516739ec9c64981ca71aa8f21b530cd90f73c68a580e87431', '02_rp_additive_data/spectra_wide.parquet': '9cae4b860cd468e3017d53f043f7632e866a22bfacfcdd082d73ab995391f005'}
DATA_BUNDLE_B64 = "..."


In [ ]:
# @title 2b. Unpack and verify the datasets
# I bundled both challenge folders inside the notebook so it runs anywhere. This cell
# writes them to disk once and checks every file against its SHA-256 hash.
DATA_ROOT = Path("/content/higher_dimensional_optical_data" if IN_COLAB
                 else "higher_dimensional_optical_data")

def bundle_errors(root):
    errors = []
    for relative, expected in DATA_BUNDLE_SHA256.items():
        path = root / relative
        if not path.is_file():
            errors.append(f"missing: {relative}")
        elif hashlib.sha256(path.read_bytes()).hexdigest() != expected:
            errors.append(f"checksum mismatch: {relative}")
    return errors

if bundle_errors(DATA_ROOT):
    shutil.rmtree(DATA_ROOT, ignore_errors=True)
    DATA_ROOT.mkdir(parents=True)
    with zipfile.ZipFile(io.BytesIO(base64.b64decode(DATA_BUNDLE_B64))) as archive:
        archive.extractall(DATA_ROOT)
    problems = bundle_errors(DATA_ROOT)
    if problems:
        raise RuntimeError("Bundled data failed verification:\n- " + "\n- ".join(problems))
    print(f"Unpacked {len(DATA_BUNDLE_SHA256)} files; every file passed SHA-256 verification.")
else:
    print("Verified data already present; nothing to unpack.")

QUATERNARY_DIR = DATA_ROOT / "01_hochan_quaternary_data"
RP_DIR = DATA_ROOT / "02_rp_additive_data"
print("Data folder:", DATA_ROOT)
print("Challenge 1 — Quaternary System: ready")
print("Challenge 2 — RP-Additive System: ready")

Unpacked 9 files; every file passed SHA-256 verification.
Data folder: /content/higher_dimensional_optical_data
Challenge 1 — Quaternary System: ready
Challenge 2 — RP-Additive System: ready


In [ ]:
# @title 3. Load the prepared tables
QUATERNARY_COMPOSITION_PATH = QUATERNARY_DIR / "composition_and_recipe.csv"
RP_COMPOSITION_PATH = RP_DIR / "composition_and_recipe.csv"

quaternary_composition = pd.read_csv(QUATERNARY_COMPOSITION_PATH)
quaternary_optical = pd.read_parquet(QUATERNARY_DIR / "optical_spectra_long.parquet")
quaternary_manifest = pd.read_csv(QUATERNARY_DIR / "measurement_manifest.csv")

rp_composition = pd.read_csv(RP_COMPOSITION_PATH)
rp_features = pd.read_parquet(RP_DIR / "metadata_features.parquet")
rp_spectra = pd.read_parquet(RP_DIR / "spectra_wide.parquet")

rp_wavelength_columns = sorted(
    (column for column in rp_spectra if column.startswith("wl_")),
    key=lambda column: float(column.split("_", 1)[1]),
)
rp_wavelengths = np.asarray([
    float(column.split("_", 1)[1]) for column in rp_wavelength_columns
])
rp_spectra_by_id = rp_spectra.set_index("spectrum_id")


In [ ]:
# @title 4. Run compact scientific-structure checks
assert len(quaternary_composition) == quaternary_composition["well"].nunique() == 96
assert set(quaternary_composition["well"]) == set(quaternary_optical["well"])
assert set(quaternary_optical["geometry"]) == {"Top", "Bottom", "Absorbance"}

a_site = ["FA_fraction", "Cs_fraction", "Rb_fraction", "DMA_fraction"]
x_site = ["I_fraction", "Br_fraction", "Cl_fraction"]
assert np.allclose(quaternary_composition[a_site].sum(axis=1), 1.0)
assert np.allclose(quaternary_composition[x_site].sum(axis=1), 1.0)

assert len(rp_composition) == rp_composition["well"].nunique() == 96
assert set(rp_composition["well"]) == set(rp_features["well"])
assert len(rp_features) == rp_features["spectrum_id"].nunique() == 3840
assert set(rp_features["spectrum_id"]) == set(rp_spectra["spectrum_id"])
assert np.allclose(
    rp_composition["spacer_host_fraction"]
    + rp_composition["FAPbI3_host_fraction"],
    1.0,
)

coverage = pd.DataFrame([
    {
        "challenge": "Challenge 1 — Quaternary System",
        "wells": quaternary_composition["well"].nunique(),
        "spectra": quaternary_optical.groupby(["well", "geometry"]).ngroups,
        "times": "none",
        "measurements": "Top PL, Bottom PL, absorbance",
    },
    {
        "challenge": "Challenge 2 — RP-Additive System",
        "wells": rp_composition["well"].nunique(),
        "spectra": len(rp_features),
        "times": rp_features["time_min"].nunique(),
        "measurements": "Top PL, Bottom PL",
    },
])
display(Markdown("### Data ready — all integrity and structure checks passed"))
display(coverage)


### Data ready — all integrity and structure checks passed

,challenge,wells,spectra,times,measurements
0,Challenge 1 — Quaternary System,96,288,none,"Top PL, Bottom PL, absorbance"
1,Challenge 2 — RP-Additive System,96,3840,20,"Top PL, Bottom PL"


## What is “high-dimensional” here?

| Challenge | Composition variables | Measurement variables | Spectral variable |
|---|---|---|---|
| Quaternary System | FA, Cs, Rb, DMA; I/Br slice | Top PL, Bottom PL, absorbance | wavelength |
| RP-Additive System | 3AMP/FAPbI3 host fraction; nominal MACl level | time; Top/Bottom PL | wavelength |

Two guardrails matter throughout:

- In the Quaternary System, **Top and Bottom are collection geometries**, not time
  points or replicates.
- In the RP-Additive System, MACl percentage is a **nominal design level with
  undocumented basis**,
  not a third closed-composition fraction.

PL peaks and spectral summaries are optical observations—not structural phase labels.

### Possible visualization strategies

There is no single required chart type. Useful solution families include:

- **small multiples:** reserve panels for composition slices, geometry, or time;
- **overview + detail:** use a composition map to navigate to complete spectra;
- **interactive controls:** let the user select a well, time, geometry, or metric;
- **change encodings:** show Top − Bottom or final − initial values with a shared scale;
- **spectral-first views:** use heatmaps, trajectories, or compact spectral glyphs.

The worked examples below use **overview + detail**. They are starting points, not the
intended final answer. Figures are stacked at full width by default so labels, legends,
and color scales stay readable in Colab.


In [ ]:
# Inspect the two one-row-per-well composition tables
display(Markdown("#### Challenge 1 — Quaternary System composition and recipe"))
display(quaternary_composition.head(6))
print("Full CSV:", QUATERNARY_COMPOSITION_PATH)

display(Markdown("#### Challenge 2 — RP-Additive System composition and recipe"))
display(rp_composition.head(6))
print("Full CSV:", RP_COMPOSITION_PATH)

#### Challenge 1 — Quaternary System composition and recipe

,well,row,col,FA_fraction,Cs_fraction,Rb_fraction,DMA_fraction,I_fraction,Br_fraction,Cl_fraction,...,Br_design_percent,total_volume_uL,FAPbI3_volume_uL,FAPbBr3_volume_uL,RbPbI3_volume_uL,DMAPbI3_volume_uL,CsPbI3_volume_uL,CsPbI05Br05_volume_uL,composition_label,composition_basis
0,A1,A,1,0.900,0.1,0.0,0.000,1.0000,0.0000,0.0,...,0.000000,100.0,90.0,0.0,0.0,0.0,10.0,0.0,FA 0.900 | Cs 0.100 | Rb 0.000 | DMA 0.000 || ...,nominal_equal_molar_stock_volume
1,A2,A,2,0.875,0.1,0.0,0.025,1.0000,0.0000,0.0,...,0.000000,100.0,87.5,0.0,0.0,2.5,10.0,0.0,FA 0.875 | Cs 0.100 | Rb 0.000 | DMA 0.025 || ...,nominal_equal_molar_stock_volume
2,A3,A,3,0.850,0.1,0.0,0.050,1.0000,0.0000,0.0,...,0.000000,100.0,85.0,0.0,0.0,5.0,10.0,0.0,FA 0.850 | Cs 0.100 | Rb 0.000 | DMA 0.050 || ...,nominal_equal_molar_stock_volume
3,A4,A,4,0.800,0.1,0.0,0.100,1.0000,0.0000,0.0,...,0.000000,100.0,80.0,0.0,0.0,10.0,10.0,0.0,FA 0.800 | Cs 0.100 | Rb 0.000 | DMA 0.100 || ...,nominal_equal_molar_stock_volume
4,A5,A,5,0.900,0.1,0.0,0.000,0.8335,0.1665,0.0,...,16.666667,100.0,75.0,15.0,0.0,0.0,6.7,3.3,FA 0.900 | Cs 0.100 | Rb 0.000 | DMA 0.000 || ...,nominal_equal_molar_stock_volume
5,A6,A,6,0.875,0.1,0.0,0.025,0.8335,0.1665,0.0,...,16.666667,100.0,72.5,15.0,0.0,2.5,6.7,3.3,FA 0.875 | Cs 0.100 | Rb 0.000 | DMA 0.025 || ...,nominal_equal_molar_stock_volume


Full CSV: /content/higher_dimensional_optical_data/01_hochan_quaternary_data/composition_and_recipe.csv


#### Challenge 2 — RP-Additive System composition and recipe

,well,row,col,library,base_spacer,additive,spacer_host_fraction,FAPbI3_host_fraction,spacer_percent,FAPbI3_percent,additive_percent,spacer_stock_volume_uL,FAPbI3_stock_volume_uL,additive_stock_volume_uL,host_total_uL,total_mix_volume_uL,composition_label,composition_basis
0,A1,A,1,3AMP-FA with MACl,3AMP,MACl,1.000000,0.000000,100.000000,0.000000,0.0,50.00,0.00,0.0,50.0,50.0,3AMP:1.00 FA:0.00 MACl:0%,host_fraction_from_nominal_stock_volume;additi...
1,A2,A,2,3AMP-FA with MACl,3AMP,MACl,0.909091,0.090909,90.909091,9.090909,0.0,45.45,4.55,0.0,50.0,50.0,3AMP:0.91 FA:0.09 MACl:0%,host_fraction_from_nominal_stock_volume;additi...
2,A3,A,3,3AMP-FA with MACl,3AMP,MACl,0.818182,0.181818,81.818182,18.181818,0.0,40.91,9.09,0.0,50.0,50.0,3AMP:0.82 FA:0.18 MACl:0%,host_fraction_from_nominal_stock_volume;additi...
3,A4,A,4,3AMP-FA with MACl,3AMP,MACl,0.727273,0.272727,72.727273,27.272727,0.0,36.36,13.64,0.0,50.0,50.0,3AMP:0.73 FA:0.27 MACl:0%,host_fraction_from_nominal_stock_volume;additi...
4,A5,A,5,3AMP-FA with MACl,3AMP,MACl,0.636364,0.363636,63.636364,36.363636,0.0,31.82,18.18,0.0,50.0,50.0,3AMP:0.64 FA:0.36 MACl:0%,host_fraction_from_nominal_stock_volume;additi...
5,A6,A,6,3AMP-FA with MACl,3AMP,MACl,0.545455,0.454545,54.545455,45.454545,0.0,27.27,22.73,0.0,50.0,50.0,3AMP:0.55 FA:0.45 MACl:0%,host_fraction_from_nominal_stock_volume;additi...


Full CSV: /content/higher_dimensional_optical_data/02_rp_additive_data/composition_and_recipe.csv


In [ ]:
# Responsive display/export helpers used by both worked examples.
# One column is the readable Colab default; use columns=2 only on a wide display.
def show_figures(figures, columns=1):
    if columns not in (1, 2):
        raise ValueError("columns must be 1 or 2")
    blocks = [
        "<div style='min-width:0;width:100%;overflow-x:auto'>"
        + pio.to_html(
            figure,
            include_plotlyjs="cdn" if index == 0 else False,
            full_html=False,
            auto_play=False,
            config={"responsive": True, "displaylogo": False},
        )
        + "</div>"
        for index, figure in enumerate(figures)
    ]
    grid_class = f"hd-figure-grid-{columns}"
    display(HTML(
        f"<style>.{grid_class}{{display:grid;grid-template-columns:repeat("
        f"{columns},minmax(0,1fr));gap:28px;align-items:start;width:100%;"
        "max-width:1200px;margin:0 auto}}"
        f"@media(max-width:1100px){{.{grid_class}{{grid-template-columns:1fr}}}}"
        "</style>"
        f"<div class='{grid_class}'>" + "".join(blocks) + "</div>"
    ))

def export_figure_grid(figures, path, title, columns=1):
    if columns not in (1, 2):
        raise ValueError("columns must be 1 or 2")
    blocks = [
        pio.to_html(
            figure,
            include_plotlyjs=True if index == 0 else False,
            full_html=False,
            auto_play=False,
            config={"responsive": True, "displaylogo": False},
        )
        for index, figure in enumerate(figures)
    ]
    document = (
        "<!doctype html><meta charset='utf-8'><title>" + escape(title) + "</title>"
        "<style>body{font-family:Arial;margin:24px;color:#172b4d}"
        ".grid{display:grid;gap:28px;max-width:1200px;margin:0 auto}"
        f".grid{{grid-template-columns:repeat({columns},minmax(0,1fr))}}"
        "@media(max-width:1100px){.grid{grid-template-columns:1fr}}"
        ".grid>div{min-width:0;width:100%;overflow-x:auto}</style>"
        "<h1>" + escape(title) + "</h1><div class='grid'>"
        + "".join("<div>" + block + "</div>" for block in blocks)
        + "</div>"
    )
    Path(path).write_text(document, encoding="utf-8")
    return Path(path)


<h2><font color="purple">2.</font> Explore the Quaternary System</h2>

### Problem 1

> **Where do Top and Bottom PL disagree across composition, and what additional
> context does absorbance provide?**

The A-site fractions **FA + Cs + Rb + DMA = 1**. The X-site fractions
**I + Br + Cl = 1** separately. Never normalize all seven fractions together.

A conventional ternary diagram is not enough because the A-site contains four
components and the plate also varies halide composition. The baseline solution uses
**small-multiple composition slices** for overview and a separate **full-spectrum
detail view** for evidence.

We will first create a small well-level feature table. These scalar features are
navigation aids; the full spectra remain the evidence.


In [ ]:
# Summarize each Quaternary System PL spectrum without changing the source data
integrate = np.trapezoid if hasattr(np, "trapezoid") else np.trapz

def summarize_pl(group):
    ordered = group.sort_values("wavelength_nm")
    wavelength = ordered["wavelength_nm"].to_numpy(float)
    raw = ordered["optical_signal_instrument_units"].to_numpy(float)
    signal = np.clip(raw - np.nanpercentile(raw, 5), 0, None)
    area = float(integrate(signal, wavelength))
    peak = float(wavelength[int(np.nanargmax(signal))])
    centroid = float(np.sum(wavelength * signal) / signal.sum())
    return pd.Series({
        "dominant_peak_nm": peak,
        "centroid_nm": centroid,
        "log10_integrated_pl": np.log10(area),
    })

quaternary_pl_features = (
    quaternary_optical[quaternary_optical["modality"].eq("PL")]
    .groupby(["well", "geometry"], sort=False)[
        ["wavelength_nm", "optical_signal_instrument_units"]
    ]
    .apply(summarize_pl)
    .reset_index()
)


In [ ]:
# Assemble one row per well for composition-space visualization
pl_wide = quaternary_pl_features.pivot(
    index="well", columns="geometry",
    values=["dominant_peak_nm", "centroid_nm", "log10_integrated_pl"],
)
pl_wide.columns = [
    f"{geometry}_{metric}" for metric, geometry in pl_wide.columns
]
pl_wide = pl_wide.reset_index()

absorbance_points = (
    quaternary_optical[
        quaternary_optical["modality"].eq("Absorbance")
        & quaternary_optical["wavelength_nm"].isin([450, 650, 750])
    ]
    .pivot(index="well", columns="wavelength_nm",
           values="optical_signal_instrument_units")
    .rename(columns=lambda value: f"Abs_signal_{int(value)}nm")
    .reset_index()
)

quaternary_features = (
    quaternary_composition.merge(pl_wide, on="well", validate="one_to_one")
    .merge(absorbance_points, on="well", validate="one_to_one")
)
quaternary_features["Top_minus_Bottom_peak_nm"] = (
    quaternary_features["Top_dominant_peak_nm"]
    - quaternary_features["Bottom_dominant_peak_nm"]
)
quaternary_features["Top_minus_Bottom_centroid_nm"] = (
    quaternary_features["Top_centroid_nm"]
    - quaternary_features["Bottom_centroid_nm"]
)
display(quaternary_features.head())


,well,row,col,FA_fraction,Cs_fraction,Rb_fraction,DMA_fraction,I_fraction,Br_fraction,Cl_fraction,...,Top_dominant_peak_nm,Bottom_centroid_nm,Top_centroid_nm,Bottom_log10_integrated_pl,Top_log10_integrated_pl,Abs_signal_450nm,Abs_signal_650nm,Abs_signal_750nm,Top_minus_Bottom_peak_nm,Top_minus_Bottom_centroid_nm
0,A1,A,1,0.900,0.1,0.0,0.000,1.0000,0.0000,0.0,...,796.0,798.670772,793.513213,5.074690,4.641999,1.137,0.784,0.638,-8.0,-5.157559
1,A2,A,2,0.875,0.1,0.0,0.025,1.0000,0.0000,0.0,...,800.0,799.003212,793.793578,5.127319,4.654614,0.982,0.944,0.818,1.0,-5.209634
2,A3,A,3,0.850,0.1,0.0,0.050,1.0000,0.0000,0.0,...,785.0,786.070694,777.495514,4.930852,4.427226,0.754,0.553,0.471,-4.0,-8.575180
3,A4,A,4,0.800,0.1,0.0,0.100,1.0000,0.0000,0.0,...,777.0,778.954967,771.642733,5.030859,4.551035,0.721,0.490,0.416,-7.0,-7.312234
4,A5,A,5,0.900,0.1,0.0,0.000,0.8335,0.1665,0.0,...,752.0,751.787562,746.566288,5.200939,4.726454,0.987,0.612,0.456,-6.0,-5.221274


In [ ]:
# Reusable Challenge 1 composition overview
QUATERNARY_METRICS = {
    "Top_minus_Bottom_peak_nm": "Top - Bottom dominant peak (nm)",
    "Top_minus_Bottom_centroid_nm": "Top - Bottom centroid (nm)",
    "Top_dominant_peak_nm": "Top dominant peak (nm)",
    "Bottom_dominant_peak_nm": "Bottom dominant peak (nm)",
    "Abs_signal_650nm": "Absorbance signal at 650 nm",
}
QUATERNARY_COLORBAR_TITLES = {
    "Top_minus_Bottom_peak_nm": "Δ peak<br>(nm)",
    "Top_minus_Bottom_centroid_nm": "Δ centroid<br>(nm)",
    "Top_dominant_peak_nm": "Top peak<br>(nm)",
    "Bottom_dominant_peak_nm": "Bottom peak<br>(nm)",
    "Abs_signal_650nm": "Absorbance<br>at 650 nm",
}

def quaternary_overview(metric="Top_minus_Bottom_peak_nm"):
    diverging = metric.startswith("Top_minus_Bottom")
    figure = px.scatter(
        quaternary_features,
        x="Rb_design_percent", y="DMA_design_percent", color=metric,
        facet_row="Cs_design_percent", facet_col="Br_design_percent",
        category_orders={
            "Cs_design_percent": sorted(
                quaternary_features["Cs_design_percent"].unique(), reverse=True
            ),
            "Br_design_percent": sorted(
                quaternary_features["Br_design_percent"].unique()
            ),
        },
        custom_data=["well", "FA_fraction", "I_fraction", "Br_fraction"],
        labels={
            "Rb_design_percent": "Rb design level (%)",
            "DMA_design_percent": "DMA design level (%)",
            metric: QUATERNARY_METRICS[metric],
        },
        color_continuous_scale="RdBu_r" if diverging else "Viridis",
        color_continuous_midpoint=0 if diverging else None,
        title=(
            "All 96 compositions"
            f"<br><sup>Color: {QUATERNARY_METRICS[metric]}</sup>"
        ),
        height=760,
    )
    figure.update_traces(
        marker={"size": 16, "line": {"color": "white", "width": 1}},
        hovertemplate=(
            "<b>Well %{customdata[0]}</b><br>Rb %{x:g}%<br>DMA %{y:g}%<br>"
            "FA %{customdata[1]:.3f}<br>I %{customdata[2]:.3f}<br>"
            "Br %{customdata[3]:.3f}<br>Value %{marker.color:.4g}<extra></extra>"
        ),
    )
    figure.for_each_annotation(
        lambda annotation: annotation.update(
            text=annotation.text
            .replace("Cs_design_percent=", "Cs = ")
            .replace("Br_design_percent=", "Br = ")
            + "%"
        )
    )
    figure.update_coloraxes(colorbar={
        "title": {
            "text": QUATERNARY_COLORBAR_TITLES[metric], "side": "right"
        },
        "thickness": 18,
        "len": 0.72,
        "x": 1.02,
    })
    figure.update_xaxes(automargin=True)
    figure.update_yaxes(automargin=True)
    figure.update_layout(
        template="plotly_white", autosize=True,
        margin={"l": 75, "r": 135, "t": 110, "b": 80},
        title={"x": 0.01, "xanchor": "left"},
    )
    return figure


In [ ]:
# Reusable Challenge 1 full-spectrum view
def quaternary_spectra(well="H8"):
    sample = quaternary_optical[quaternary_optical["well"].eq(well)]
    composition = quaternary_composition[
        quaternary_composition["well"].eq(well)
    ].iloc[0]
    figure = make_subplots(
        rows=2, cols=1, vertical_spacing=0.18,
        subplot_titles=("Top and Bottom PL shape", "Absorbance channel"),
    )
    for geometry, color in [("Top", "#2563eb"), ("Bottom", "#f97316")]:
        rows = sample[sample["geometry"].eq(geometry)].sort_values("wavelength_nm")
        wavelength = rows["wavelength_nm"].to_numpy(float)
        raw = rows["optical_signal_instrument_units"].to_numpy(float)
        signal = np.clip(raw - np.nanpercentile(raw, 5), 0, None)
        signal = signal / signal.max()
        figure.add_trace(go.Scatter(
            x=wavelength, y=signal, mode="lines", name=f"{geometry} PL",
            line={"color": color, "width": 2.5},
        ), row=1, col=1)

    absorbance = sample[sample["geometry"].eq("Absorbance")].sort_values("wavelength_nm")
    figure.add_trace(go.Scatter(
        x=absorbance["wavelength_nm"],
        y=absorbance["optical_signal_instrument_units"],
        mode="lines", name="Absorbance", line={"color": "#059669", "width": 2.5},
    ), row=2, col=1)
    subtitle = (
        f"FA {composition.FA_fraction:.3f} | Cs {composition.Cs_fraction:.3f} | "
        f"Rb {composition.Rb_fraction:.3f} | DMA {composition.DMA_fraction:.3f} | "
        f"I {composition.I_fraction:.3f} | Br {composition.Br_fraction:.3f}"
    )
    figure.update_xaxes(title_text="Wavelength (nm)", row=2, col=1)
    figure.update_yaxes(title_text="Peak-normalized PL", row=1, col=1)
    figure.update_yaxes(title_text="Instrument units", row=2, col=1)
    figure.update_layout(
        title=f"Well {well}<br><sup>{subtitle}</sup>", height=760,
        template="plotly_white", hovermode="x unified", autosize=True,
        margin={"l": 85, "r": 45, "t": 105, "b": 75},
        title_x=0.01,
    )
    return figure


# Worked Example — Quaternary System

### Question

Where do Top and Bottom PL have different dominant peaks, and what do the complete
spectra look like at one selected composition?

### Baseline solution

The overview uses small multiples for Cs and Br, Rb/DMA position, and color for the
optical difference. The second figure shows Top PL, Bottom PL, and absorbance for well
H8. Hover retains the well and composition details. The figures are intentionally
stacked so neither is squeezed into half of the notebook width.


In [ ]:
QUATERNARY_EXAMPLE_WELL = "H8"
quaternary_example_figures = [
    quaternary_overview("Top_minus_Bottom_peak_nm"),
    quaternary_spectra(QUATERNARY_EXAMPLE_WELL),
]
show_figures(quaternary_example_figures)

record = quaternary_features[
    quaternary_features["well"].eq(QUATERNARY_EXAMPLE_WELL)
].iloc[0]
display(Markdown(f'''
### What did we just do?

At **{QUATERNARY_EXAMPLE_WELL}**, the Top-minus-Bottom
dominant-peak difference is **{record.Top_minus_Bottom_peak_nm:+.0f} nm**, while the
centroid difference is **{record.Top_minus_Bottom_centroid_nm:+.2f} nm**. Those two
summaries can even disagree in sign, which is why the full line shapes remain visible.
This is an optical comparison, not a phase assignment.
'''))



### What did we just do?

At **H8**, the Top-minus-Bottom
dominant-peak difference is **+11 nm**, while the
centroid difference is **-2.89 nm**. Those two
summaries can even disagree in sign, which is why the full line shapes remain visible.
This is an optical comparison, not a phase assignment.


# <font color="red">Challenge 1 — Quaternary System</font>

### Your task

Improve the baseline so a new user can connect the four A-site fractions, halide
level, measurement geometry, and full spectra more quickly or more accurately.

### Possible solutions

- add coordinated selection between the overview and spectrum;
- try tetrahedral slices or a different composition encoding;
- make absorbance context more direct;
- compare several wells or geometries without losing the full line shapes;
- build a wavelength-first map or compact spectral glyph view.

### Scientific question

> What trend can a new user discover in 60 seconds, and which spectrum supports it?

### Minimum deliverable

One readable visualization, one evidence-bearing spectrum, one sentence describing the
insight, and one sentence naming a possible misinterpretation.


## <font color="green">How I approached Challenge 1</font>

Before building anything I plotted a lot of the raw Top and Bottom PL spectra. Two things jumped out at me:

- **The baseline's biggest Top − Bottom peak differences are not real.** In D4 and H12 the Top read has a
  single-pixel spike right at 850 nm, so `argmax` puts the "dominant peak" at the detector edge
  (+58 nm and +155 nm in the baseline map). The actual bands are where the Bottom bands are.
- **The weak Top reads carry a higher flat background at 400–520 nm.** A centroid over the full 401–850 nm
  range gets pulled blue by that background, which is why the baseline centroid split looks like −20 to −29 nm
  for the dim pure-iodide wells.

So my plan was:

1. **Robust features first** — light smoothing, subtract the 420–520 nm background, search for the peak only
   in 600–840 nm, and take the centroid within ±50 nm of the peak. For absorbance I find the steepest drop in a
   window around the PL peak.
2. **One overview that keeps every spectrum** — I noticed the plate layout *is* the design: rows = Cs × Rb,
   columns = Br × DMA. So I drew all 96 wells as small spectral glyphs (Top, Bottom and absorbance in every cell)
   in exactly that grid, with the cell background showing brightness.
3. **One trend plot** that turns the overview into numbers (peak and brightness vs DMA, split by Br, Cs and Rb).
4. **A sanity-check plot** comparing the baseline Top/Bottom differences with mine.
5. **Evidence spectra** for the trend, plus a dropdown explorer so any of the 96 wells can be inspected in full.


In [ ]:
# ------------------------------------------------------------
# My Challenge 1, step 1: more robust spectral features
# ------------------------------------------------------------
# When I looked at the raw spectra I noticed two things the baseline features
# don't handle well:
#   (1) the weak Top PL reads have single-pixel spikes right at the 850 nm end of
#       the detector, so "argmax" sometimes lands at 850 nm (D4 and H12), and
#   (2) the Top reads carry a higher flat background at the blue end (400-520 nm).
#       A centroid taken over the full 401-850 nm range gets dragged blue by that
#       background, even when the emission band itself has not moved.
# So I smooth lightly, subtract the 420-520 nm background, search for the peak
# only inside 600-840 nm, and take the centroid inside +/-50 nm of the peak.
# For absorbance I look for the steepest drop in a window around the PL peak
# (that is where the band edge should be) and also record the step height.

def moving_average(y, k):
    pad = k // 2
    return np.convolve(np.pad(y, pad, mode="edge"), np.ones(k) / k, mode="valid")

def robust_pl_features(group):
    ordered = group.sort_values("wavelength_nm")
    x = ordered["wavelength_nm"].to_numpy(float)
    raw = ordered["optical_signal_instrument_units"].to_numpy(float)
    blue = (x >= 420) & (x <= 520)
    background = float(np.median(raw[blue]))
    signal = np.clip(moving_average(raw, 7) - background, 0, None)
    search = (x >= 600) & (x <= 840)
    i = int(np.argmax(np.where(search, signal, -1)))
    peak, height = float(x[i]), float(signal[i])
    window = (x >= peak - 50) & (x <= peak + 50)
    centroid = float(np.sum(x[window] * signal[window]) / signal[window].sum())
    half = x[search & (signal >= height / 2)]
    noise = float(np.std(raw[blue])) + 1.0
    clean = np.clip(raw - background, 0, None)
    return pd.Series({
        "robust_peak_nm": peak,
        "window_centroid_nm": centroid,
        "fwhm_nm": float(half.max() - half.min()),
        "peak_height": height,
        "snr": height / noise,
        "blue_background": background,
        "log10_band_area": float(np.log10(integrate(clean[search], x[search]))),
    })

quaternary_robust = (
    quaternary_optical[quaternary_optical["modality"].eq("PL")]
    .groupby(["well", "geometry"], sort=False)[
        ["wavelength_nm", "optical_signal_instrument_units"]
    ]
    .apply(robust_pl_features)
    .reset_index()
)
robust_wide = quaternary_robust.pivot(index="well", columns="geometry")
robust_wide.columns = [f"{geometry}_{metric}" for metric, geometry in robust_wide.columns]
robust_wide = robust_wide.reset_index()

absorbance_matrix = (
    quaternary_optical[quaternary_optical["geometry"].eq("Absorbance")]
    .pivot(index="well", columns="wavelength_nm", values="optical_signal_instrument_units")
)
abs_wavelength = absorbance_matrix.columns.to_numpy(float)
bottom_peak_lookup = robust_wide.set_index("well")["Bottom_robust_peak_nm"]
edge_rows = []
for well, values in absorbance_matrix.iterrows():
    smooth_abs = moving_average(values.to_numpy(float), 15)
    slope = np.gradient(smooth_abs, abs_wavelength)
    pl_peak = bottom_peak_lookup[well]
    near = (abs_wavelength >= pl_peak - 80) & (abs_wavelength <= pl_peak + 30)
    j = int(np.argmin(np.where(near, slope, np.inf)))
    edge_rows.append({
        "well": well,
        "abs_edge_nm": float(abs_wavelength[j]),
        "abs_step_at_PL": float(np.interp(pl_peak - 40, abs_wavelength, smooth_abs)
                                 - np.interp(pl_peak + 40, abs_wavelength, smooth_abs)),
        "abs_at_500nm": float(np.interp(500, abs_wavelength, smooth_abs)),
    })

q = (
    quaternary_features
    .merge(robust_wide, on="well", validate="one_to_one")
    .merge(pd.DataFrame(edge_rows), on="well", validate="one_to_one")
)
q["robust_Top_minus_Bottom_peak_nm"] = q["Top_robust_peak_nm"] - q["Bottom_robust_peak_nm"]
q["robust_Top_minus_Bottom_centroid_nm"] = q["Top_window_centroid_nm"] - q["Bottom_window_centroid_nm"]
q["Bottom_over_Top_band_area"] = 10 ** (q["Bottom_log10_band_area"] - q["Top_log10_band_area"])
q["PL_peak_minus_abs_edge_nm"] = q["Bottom_robust_peak_nm"] - q["abs_edge_nm"]
q["weak_Top_PL"] = q["Top_snr"] < 75   # flag for the dimmest Top reads

display(Markdown("**My robust feature table (first rows):**"))
display(q[[
    "well", "Cs_design_percent", "Rb_design_percent", "DMA_design_percent", "Br_design_percent",
    "Top_dominant_peak_nm", "Top_robust_peak_nm", "Bottom_robust_peak_nm",
    "robust_Top_minus_Bottom_peak_nm", "Top_minus_Bottom_centroid_nm",
    "robust_Top_minus_Bottom_centroid_nm", "Bottom_over_Top_band_area", "abs_edge_nm",
]].round(2).head(8))


**My robust feature table (first rows):**

,well,Cs_design_percent,Rb_design_percent,DMA_design_percent,Br_design_percent,Top_dominant_peak_nm,Top_robust_peak_nm,Bottom_robust_peak_nm,robust_Top_minus_Bottom_peak_nm,Top_minus_Bottom_centroid_nm,robust_Top_minus_Bottom_centroid_nm,Bottom_over_Top_band_area,abs_edge_nm
0,A1,10.0,0.0,0.0,0.00,796.0,799.0,801.0,-2.0,-5.16,-1.37,2.76,797.0
1,A2,10.0,0.0,2.5,0.00,800.0,799.0,802.0,-3.0,-5.21,-1.54,3.02,798.0
2,A3,10.0,0.0,5.0,0.00,785.0,785.0,788.0,-3.0,-8.58,-1.45,3.33,790.0
3,A4,10.0,0.0,10.0,0.00,777.0,777.0,781.0,-4.0,-7.31,-1.36,3.18,775.0
4,A5,10.0,0.0,0.0,16.67,752.0,751.0,752.0,-1.0,-5.22,-0.24,3.13,751.0
5,A6,10.0,0.0,2.5,16.67,748.0,749.0,752.0,-3.0,-3.51,-0.57,2.98,750.0
6,A7,10.0,0.0,5.0,16.67,746.0,746.0,746.0,0.0,-1.65,0.22,2.60,739.0
7,A8,10.0,0.0,10.0,16.67,740.0,741.0,742.0,-1.0,-3.23,-0.20,2.87,731.0


In [ ]:
# ------------------------------------------------------------
# My Challenge 1, step 2: a "spectral glyph map" of the whole plate
# ------------------------------------------------------------
# Instead of reducing every well to one colored dot, I draw the actual spectra of
# all 96 wells in one figure. Each tiny cell is one composition:
#   * columns: Br level (3 big blocks) x DMA level (4 cells per block)
#   * rows:    Cs level (2 big blocks) x Rb level (4 cells per block)
#   * inside a cell: Bottom PL (orange), Top PL (blue, dashed) and absorbance
#     (green), all on the same 650-850 nm axis; the light gray guides sit at
#     700, 750 and 800 nm so a peak shift can be read by eye.
#   * the cell background is the Bottom PL brightness (log10 band area), so dim
#     and bright compositions are visible without hiding the line shapes.
# Hovering on any line gives the well, its full composition and the value.

GLYPH_RANGE = (650.0, 850.0)

def _glyph_positions(table):
    cs = sorted(table["Cs_design_percent"].unique())
    rb = sorted(table["Rb_design_percent"].unique())
    br = sorted(table["Br_design_percent"].unique())
    dma = sorted(table["DMA_design_percent"].unique())
    col = table["Br_design_percent"].map({v: i for i, v in enumerate(br)}) * len(dma) \
        + table["DMA_design_percent"].map({v: i for i, v in enumerate(dma)})
    row = table["Cs_design_percent"].map({v: i for i, v in enumerate(cs)}) * len(rb) \
        + table["Rb_design_percent"].map({v: i for i, v in enumerate(rb)})
    return col.astype(int), row.astype(int), cs, rb, br, dma

def quaternary_glyph_map(table=None):
    table = (q if table is None else table).copy()
    table["gcol"], table["grow"], cs, rb, br, dma = _glyph_positions(table)
    n_cols, n_rows = int(table["gcol"].max()) + 1, int(table["grow"].max()) + 1
    lo, hi = GLYPH_RANGE

    def to_x(cell, wavelength):
        return cell + 0.06 + 0.88 * (wavelength - lo) / (hi - lo)

    def to_y(cell, value):
        return cell + 0.92 - 0.82 * value     # y axis runs downward (row A on top)

    traces = {
        "Bottom PL": dict(color="#ea580c", width=1.6, dash="solid"),
        "Top PL": dict(color="#2563eb", width=1.3, dash="dot"),
        "Absorbance": dict(color="#059669", width=1.2, dash="solid"),
    }
    xs = {k: [] for k in traces}; ys = {k: [] for k in traces}; cd = {k: [] for k in traces}
    for _, rec in table.iterrows():
        sample = quaternary_optical[quaternary_optical["well"].eq(rec.well)]
        for geometry, name in [("Bottom", "Bottom PL"), ("Top", "Top PL"), ("Absorbance", "Absorbance")]:
            s = sample[sample["geometry"].eq(geometry)].sort_values("wavelength_nm")
            x = s["wavelength_nm"].to_numpy(float)
            y = s["optical_signal_instrument_units"].to_numpy(float)
            keep = (x >= lo) & (x <= hi)
            x, y = x[keep], y[keep]
            if geometry == "Absorbance":
                ys_norm = (y - y.min()) / (y.max() - y.min() + 1e-12)
            else:
                full = s["optical_signal_instrument_units"].to_numpy(float)
                full_x = s["wavelength_nm"].to_numpy(float)
                bg = np.median(full[(full_x >= 420) & (full_x <= 520)])
                sm = np.clip(moving_average(y, 5) - bg, 0, None)
                ys_norm = sm / (sm.max() + 1e-12)
            xs[name] += list(np.round(to_x(rec.gcol, x), 4)) + [None]
            ys[name] += list(np.round(to_y(rec.grow, ys_norm), 4)) + [None]
            cd[name] += [[rec.well, int(w), round(float(v), 3)] for w, v in zip(x, y)] + [[None, None, None]]

    figure = go.Figure()
    brightness = np.full((n_rows, n_cols), np.nan)
    hover_text = np.empty((n_rows, n_cols), dtype=object)
    for _, rec in table.iterrows():
        brightness[rec.grow, rec.gcol] = rec.Bottom_log10_band_area
        hover_text[rec.grow, rec.gcol] = (
            f"Well {rec.well}<br>FA {rec.FA_fraction:.3f} | Cs {rec.Cs_fraction:.3f} | "
            f"Rb {rec.Rb_fraction:.3f} | DMA {rec.DMA_fraction:.3f}<br>"
            f"I {rec.I_fraction:.3f} | Br {rec.Br_fraction:.3f}"
            f"<br>Bottom PL peak {rec.Bottom_robust_peak_nm:.0f} nm"
            f"<br>Top PL peak {rec.Top_robust_peak_nm:.0f} nm"
            f"<br>Bottom/Top band area {rec.Bottom_over_Top_band_area:.1f}x"
            f"<br>log10 Bottom band area {rec.Bottom_log10_band_area:.2f}")
    figure.add_trace(go.Heatmap(
        z=brightness, x=np.arange(n_cols) + 0.5, y=np.arange(n_rows) + 0.5,
        colorscale=[[0, "#f8fafc"], [0.5, "#e0e7ff"], [1, "#c7d2fe"]],
        text=hover_text, hovertemplate="%{text}<extra></extra>",
        colorbar={"title": {"text": "Bottom PL<br>brightness<br>(log10 area)", "side": "right"},
                  "thickness": 14, "len": 0.55, "x": 1.01, "y": 0.72},
        xgap=2, ygap=2, showscale=True, name="brightness",
    ))
    # guide lines at 700 / 750 / 800 nm inside every cell
    gx, gy = [], []
    for c in range(n_cols):
        for r in range(n_rows):
            for guide in (700, 750, 800):
                gx += [to_x(c, guide), to_x(c, guide), None]
                gy += [r + 0.10, r + 0.92, None]
    figure.add_trace(go.Scatter(x=gx, y=gy, mode="lines", hoverinfo="skip",
                                line={"color": "rgba(100,116,139,0.35)", "width": 0.7},
                                showlegend=False))
    for name, style in [("Absorbance", traces["Absorbance"]), ("Top PL", traces["Top PL"]),
                        ("Bottom PL", traces["Bottom PL"])]:
        figure.add_trace(go.Scatter(
            x=xs[name], y=ys[name], mode="lines", name=name, line=style,
            customdata=cd[name], connectgaps=False,
            hovertemplate=f"<b>{name}</b> · well %{{customdata[0]}}<br>"
                          "%{customdata[1]:.0f} nm: %{customdata[2]:.4g}<br>"
                          "(hover the cell background for the composition)<extra></extra>",
        ))
    # block separators
    for c in range(len(dma), n_cols, len(dma)):
        figure.add_shape(type="line", x0=c, x1=c, y0=0, y1=n_rows, line={"color": "#334155", "width": 2})
    for r in range(len(rb), n_rows, len(rb)):
        figure.add_shape(type="line", x0=0, x1=n_cols, y0=r, y1=r, line={"color": "#334155", "width": 2})
    for i, value in enumerate(br):
        figure.add_annotation(x=i * len(dma) + len(dma) / 2, y=-0.05, yref="y", showarrow=False,
                              text=f"<b>Br {value:.1f}%</b>", yanchor="bottom", font={"size": 14})
    figure.update_xaxes(
        range=[0, n_cols], tickvals=np.arange(n_cols) + 0.5,
        ticktext=[f"DMA {d:g}%" for _ in br for d in dma], tickangle=-45,
        showgrid=False, zeroline=False, side="bottom",
    )
    figure.update_yaxes(
        range=[n_rows, -0.55], tickvals=np.arange(n_rows) + 0.5,
        ticktext=[f"Cs {c:g}% · Rb {r:g}%" for c in cs for r in rb],
        showgrid=False, zeroline=False,
    )
    figure.update_layout(
        title=("All 96 compositions with their full spectra (650–850 nm in every cell)"
               "<br><sup>Orange = Bottom PL, blue dotted = Top PL, green = absorbance (each "
               "scaled 0–1 inside its cell); gray guides at 700/750/800 nm; "
               "background = Bottom PL brightness</sup>"),
        template="plotly_white", height=820, autosize=True,
        margin={"l": 130, "r": 120, "t": 110, "b": 110}, title_x=0.01,
        legend={"orientation": "h", "y": -0.16, "x": 0},
        hoverlabel={"align": "left"},
    )
    return figure


In [ ]:
# ------------------------------------------------------------
# My Challenge 1, step 3: the trend view, the sanity check, and the evidence view
# ------------------------------------------------------------
RB_COLORS = {0.0: "#94a3b8", 2.5: "#60a5fa", 5.0: "#2563eb", 10.0: "#1e3a8a"}
CS_DASH = {10.0: "solid", 30.0: "dash"}

def quaternary_trend_figure():
    """Bottom PL peak and brightness versus DMA, one panel per Br level."""
    br_levels = sorted(q["Br_design_percent"].unique())
    figure = make_subplots(
        rows=2, cols=len(br_levels), shared_xaxes=True, vertical_spacing=0.10,
        horizontal_spacing=0.06,
        subplot_titles=[f"Br {b:.1f}%" for b in br_levels] + [""] * len(br_levels),
    )
    for c, br in enumerate(br_levels, start=1):
        for (cs, rb), grp in q[q["Br_design_percent"].eq(br)].groupby(
                ["Cs_design_percent", "Rb_design_percent"]):
            grp = grp.sort_values("DMA_design_percent")
            name = f"Cs {cs:g}% · Rb {rb:g}%"
            common = dict(
                mode="lines+markers", name=name, legendgroup=name, showlegend=(c == 1),
                line={"color": RB_COLORS[rb], "dash": CS_DASH[cs], "width": 2},
                marker={"size": 7, "symbol": "circle" if cs == 10 else "diamond"},
                customdata=grp[["well", "Top_robust_peak_nm", "abs_edge_nm"]],
            )
            figure.add_trace(go.Scatter(
                x=grp["DMA_design_percent"], y=grp["Bottom_robust_peak_nm"], **common,
                hovertemplate=("Well %{customdata[0]}<br>DMA %{x:g}%<br>Bottom peak %{y:.0f} nm"
                               "<br>Top peak %{customdata[1]:.0f} nm"
                               "<br>abs. edge ≈ %{customdata[2]:.0f} nm<extra>" + name + "</extra>"),
            ), row=1, col=c)
            figure.add_trace(go.Scatter(
                x=grp["DMA_design_percent"], y=grp["Bottom_log10_band_area"],
                **{**common, "showlegend": False},
                hovertemplate=("Well %{customdata[0]}<br>DMA %{x:g}%<br>log10 Bottom area %{y:.2f}"
                               "<extra>" + name + "</extra>"),
            ), row=2, col=c)
    figure.update_yaxes(title_text="Bottom PL peak (nm)", row=1, col=1)
    figure.update_yaxes(title_text="log10 Bottom PL band area", row=2, col=1)
    for c in range(1, len(br_levels) + 1):
        figure.update_xaxes(title_text="DMA design level (%)", tickvals=[0, 2.5, 5, 10], row=2, col=c)
        if c > 1:
            figure.update_yaxes(matches="y4", row=2, col=c)
    figure.update_layout(
        title=("Br sets the emission colour; DMA and Cs fine-tune it; Rb + DMA dims pure-iodide films"
               "<br><sup>Lines = one Cs/Rb series across DMA. Colour = Rb level, dashed/diamond = Cs 30%. "
               "Peaks from smoothed, background-subtracted Bottom PL (600–840 nm search)</sup>"),
        template="plotly_white", height=760, autosize=True, title_x=0.01,
        margin={"l": 80, "r": 40, "t": 110, "b": 70},
        legend={"orientation": "h", "y": -0.12, "x": 0},
    )
    return figure


def quaternary_sanity_check_figure():
    """Shows why the baseline Top-Bottom summaries exaggerate the disagreement."""
    figure = make_subplots(
        rows=1, cols=2, horizontal_spacing=0.12,
        subplot_titles=(
            "Dominant peak: baseline vs. my robust peak",
            "Full-range centroid split vs. Top blue-end background",
        ),
    )
    colors = np.where(q["weak_Top_PL"], "#dc2626", "#64748b")
    figure.add_trace(go.Scatter(
        x=q["Top_minus_Bottom_peak_nm"], y=q["robust_Top_minus_Bottom_peak_nm"],
        mode="markers+text", text=np.where(q["Top_minus_Bottom_peak_nm"].abs() > 15, q["well"], ""),
        textposition="top center", marker={"size": 9, "color": colors},
        customdata=q[["well"]], showlegend=False,
        hovertemplate="Well %{customdata[0]}<br>baseline Δpeak %{x:.0f} nm"
                      "<br>robust Δpeak %{y:.0f} nm<extra></extra>",
    ), row=1, col=1)
    ratio = q["Top_blue_background"] / q["Top_peak_height"]
    figure.add_trace(go.Scatter(
        x=ratio, y=q["Top_minus_Bottom_centroid_nm"], mode="markers",
        marker={"size": 9, "color": colors}, name="baseline full-range centroid split",
        customdata=q[["well", "robust_Top_minus_Bottom_centroid_nm"]],
        hovertemplate="Well %{customdata[0]}<br>Top background / Top peak %{x:.3f}"
                      "<br>baseline centroid split %{y:.1f} nm"
                      "<br>my windowed centroid split %{customdata[1]:.1f} nm<extra></extra>",
    ), row=1, col=2)
    figure.add_trace(go.Scatter(
        x=ratio, y=q["robust_Top_minus_Bottom_centroid_nm"], mode="markers",
        marker={"size": 7, "color": "#16a34a", "symbol": "diamond"},
        name="my ±50 nm windowed centroid split",
        hovertemplate="windowed split %{y:.1f} nm<extra></extra>",
    ), row=1, col=2)
    figure.update_xaxes(title_text="Baseline Top − Bottom dominant peak (nm)", row=1, col=1)
    figure.update_yaxes(title_text="Robust Top − Bottom peak (nm)", row=1, col=1)
    figure.update_xaxes(title_text="Top blue-end background ÷ Top band height", type="log", row=1, col=2)
    figure.update_yaxes(title_text="Top − Bottom centroid (nm)", row=1, col=2)
    figure.update_layout(
        title=("Sanity check: most of the apparent Top/Bottom disagreement is a weak-signal artifact"
               "<br><sup>Red = weak Top PL reads (SNR < 75). Edge spikes at 850 nm and the blue-end "
               "background drive the large baseline differences</sup>"),
        template="plotly_white", height=520, autosize=True, title_x=0.01,
        margin={"l": 80, "r": 40, "t": 110, "b": 110},
        legend={"orientation": "h", "y": -0.25, "x": 0.5},
    )
    return figure


def quaternary_compare_spectra(wells, title, colors=None):
    """Full-range evidence: Bottom (solid) and Top (dotted) PL plus absorbance."""
    palette = colors or ["#7c3aed", "#ea580c", "#059669", "#2563eb", "#db2777", "#475569"]
    figure = make_subplots(rows=2, cols=1, shared_xaxes=False, vertical_spacing=0.16,
                           subplot_titles=("PL (each spectrum scaled to its own max; raw max in legend)",
                                           "Absorbance (instrument units)"))
    for color, well in zip(palette, wells):
        sample = quaternary_optical[quaternary_optical["well"].eq(well)]
        rec = q[q["well"].eq(well)].iloc[0]
        tag = (f"{well}: Cs{rec.Cs_design_percent:g} Rb{rec.Rb_design_percent:g} "
               f"DMA{rec.DMA_design_percent:g} Br{rec.Br_design_percent:.0f}")
        for geometry, dash in [("Bottom", "solid"), ("Top", "dot")]:
            s = sample[sample["geometry"].eq(geometry)].sort_values("wavelength_nm")
            x = s["wavelength_nm"].to_numpy(float); y = s["optical_signal_instrument_units"].to_numpy(float)
            bg = np.median(y[(x >= 420) & (x <= 520)])
            sm = np.clip(moving_average(y, 5) - bg, 0, None)
            figure.add_trace(go.Scatter(
                x=x, y=sm / sm.max(), mode="lines", line={"color": color, "dash": dash, "width": 2},
                name=f"{tag} · {geometry} (max {y.max():.0f})", legendgroup=well,
                hovertemplate=f"{well} {geometry}<br>%{{x:.0f}} nm: %{{y:.3f}}<extra></extra>",
            ), row=1, col=1)
        a = sample[sample["geometry"].eq("Absorbance")].sort_values("wavelength_nm")
        figure.add_trace(go.Scatter(
            x=a["wavelength_nm"], y=a["optical_signal_instrument_units"], mode="lines",
            line={"color": color, "width": 2}, name=f"{well} absorbance", legendgroup=well,
            showlegend=False,
            hovertemplate=f"{well} absorbance<br>%{{x:.0f}} nm: %{{y:.3f}}<extra></extra>",
        ), row=2, col=1)
        figure.add_vline(x=rec.Bottom_robust_peak_nm, line={"color": color, "width": 1, "dash": "dash"},
                         row=2, col=1)
    figure.update_xaxes(title_text="Wavelength (nm)", range=[600, 850], row=1, col=1)
    figure.update_xaxes(title_text="Wavelength (nm)  (dashed lines = Bottom PL peak of each well)",
                        range=[350, 850], row=2, col=1)
    figure.update_yaxes(title_text="Scaled PL", row=1, col=1)
    figure.update_yaxes(title_text="Instrument units", row=2, col=1)
    figure.update_layout(title=title, template="plotly_white", height=820, autosize=True,
                         title_x=0.01, margin={"l": 80, "r": 40, "t": 100, "b": 150},
                         legend={"orientation": "h", "y": -0.12, "x": 0, "font": {"size": 11}},
                         hovermode="x unified")
    return figure


def quaternary_well_explorer(default_well="A1"):
    """Dropdown over all 96 wells so every spectrum stays reachable (works in exported HTML)."""
    wells = q.sort_values(["Cs_design_percent", "Rb_design_percent", "Br_design_percent",
                           "DMA_design_percent"])["well"].tolist()
    figure = make_subplots(rows=2, cols=1, vertical_spacing=0.15,
                           subplot_titles=("Top and Bottom PL (raw instrument units)", "Absorbance"))
    for well in wells:
        sample = quaternary_optical[quaternary_optical["well"].eq(well)]
        visible = well == default_well
        for geometry, color, dash in [("Bottom", "#ea580c", "solid"), ("Top", "#2563eb", "dot")]:
            s = sample[sample["geometry"].eq(geometry)].sort_values("wavelength_nm")
            figure.add_trace(go.Scatter(x=s["wavelength_nm"], y=s["optical_signal_instrument_units"],
                                        mode="lines", name=f"{geometry} PL", visible=visible,
                                        line={"color": color, "dash": dash, "width": 2}), row=1, col=1)
        a = sample[sample["geometry"].eq("Absorbance")].sort_values("wavelength_nm")
        figure.add_trace(go.Scatter(x=a["wavelength_nm"], y=a["optical_signal_instrument_units"],
                                    mode="lines", name="Absorbance", visible=visible,
                                    line={"color": "#059669", "width": 2}), row=2, col=1)
    buttons = []
    for i, well in enumerate(wells):
        rec = q[q["well"].eq(well)].iloc[0]
        vis = [False] * (3 * len(wells)); vis[3 * i:3 * i + 3] = [True] * 3
        buttons.append({"method": "update", "label": well, "args": [
            {"visible": vis},
            {"title": {"text": (f"Well {well}: FA {rec.FA_fraction:.3f} | Cs {rec.Cs_fraction:.3f} | "
                                f"Rb {rec.Rb_fraction:.3f} | DMA {rec.DMA_fraction:.3f} | "
                                f"Br {rec.Br_fraction:.3f}<br><sup>Bottom peak "
                                f"{rec.Bottom_robust_peak_nm:.0f} nm, Top peak {rec.Top_robust_peak_nm:.0f} nm, "
                                f"Bottom/Top band area {rec.Bottom_over_Top_band_area:.1f}x</sup>"),
                       "x": 0.01}}]})
    default_index = wells.index(default_well)
    figure.update_layout(
        updatemenus=[{"buttons": buttons, "active": default_index, "x": 1.0, "xanchor": "right",
                      "y": 1.13, "yanchor": "top", "direction": "down"}],
        template="plotly_white", height=760, autosize=True, title_x=0.01,
        margin={"l": 80, "r": 40, "t": 120, "b": 70}, hovermode="x unified",
    )
    figure.layout.title = buttons[default_index]["args"][1]["title"]
    figure.update_xaxes(title_text="Wavelength (nm)")
    figure.update_yaxes(title_text="Instrument units")
    return figure


In [ ]:
# ============================================================
# YOUR CODE STARTS HERE — Challenge 1
# ============================================================

CHALLENGE1_METRIC = "Top_minus_Bottom_peak_nm"   # kept for reference to the baseline
CHALLENGE1_WELL = "A1"

# My final Challenge 1 answer = overview (glyph map) + trend + sanity check + evidence + explorer.
challenge1_figures = [
    quaternary_glyph_map(),
    quaternary_trend_figure(),
    quaternary_sanity_check_figure(),   # is the baseline Top-vs-Bottom "disagreement" real?
    quaternary_compare_spectra(
        ["A1", "A5", "A9"],
        "Evidence 1 — the Br ladder at Cs 10%, Rb 0%, DMA 0% (wells A1 → A5 → A9)"
        "<br><sup>The whole band and the absorbance edge move together; Top (dotted) and "
        "Bottom (solid) overlap</sup>",
    ),
    quaternary_compare_spectra(
        ["A1", "A4", "E1", "H2"],
        "Evidence 2 — pure-iodide wells: DMA and Cs blue-shift the band, Rb + DMA make it dim"
        "<br><sup>A1 (reference) · A4 (+10% DMA) · E1 (Cs 30%) · H2 (Cs 30%, Rb 10%, DMA 2.5%); "
        "raw maxima are in the legend</sup>",
    ),
    quaternary_well_explorer(CHALLENGE1_WELL),
]

# Numbers I quote in my written answer (computed, not typed by hand)
by_br = q.groupby("Br_design_percent")["Bottom_robust_peak_nm"].mean()
iodide = q[q["Br_design_percent"].eq(0)]
# DMA effect inside each Br/Cs/Rb series (series mean removed, then a straight-line fit)
series = ["Br_design_percent", "Cs_design_percent", "Rb_design_percent"]
peak_resid = q["Bottom_robust_peak_nm"] - q.groupby(series)["Bottom_robust_peak_nm"].transform("mean")
dma_slope = np.polyfit(q["DMA_design_percent"], peak_resid, 1)[0]   # nm per % DMA
cs_shift_iodide = (iodide.groupby("Cs_design_percent")["Bottom_robust_peak_nm"].mean().diff().iloc[-1])
within5 = (q["robust_Top_minus_Bottom_peak_nm"].abs() <= 5).mean()
iodide_rb_dma = iodide[(iodide["Rb_design_percent"] >= 5) & (iodide["DMA_design_percent"] > 0)]
others = q[~q.index.isin(iodide_rb_dma.index)]
challenge1_numbers = {
    "peak_Br0": by_br.iloc[0], "peak_Br17": by_br.iloc[1], "peak_Br33": by_br.iloc[2],
    "dma_slope": dma_slope, "cs_shift_iodide": cs_shift_iodide,
    "median_robust_dpeak": q["robust_Top_minus_Bottom_peak_nm"].median(),
    "within5": within5,
    "median_robust_dcentroid": q["robust_Top_minus_Bottom_centroid_nm"].median(),
    "median_ratio": q["Bottom_over_Top_band_area"].median(),
    "dim_area": iodide_rb_dma["Bottom_log10_band_area"].mean(),
    "other_area": others["Bottom_log10_band_area"].mean(),
    "baseline_D4": q.set_index("well").loc["D4", "Top_minus_Bottom_peak_nm"],
    "baseline_H12": q.set_index("well").loc["H12", "Top_minus_Bottom_peak_nm"],
    "robust_D4": q.set_index("well").loc["D4", "robust_Top_minus_Bottom_peak_nm"],
    "robust_H12": q.set_index("well").loc["H12", "robust_Top_minus_Bottom_peak_nm"],
}
display(pd.Series(challenge1_numbers).round(3).to_frame("value"))

# ============================================================
# YOUR CODE ENDS HERE
# ============================================================
show_figures(challenge1_figures)


,value
peak_Br0,788.688
peak_Br17,745.688
peak_Br33,701.656
dma_slope,-1.318
cs_shift_iodide,-12.250
median_robust_dpeak,-1.000
within5,0.948
median_robust_dcentroid,-1.075
median_ratio,3.160
dim_area,4.414


## <font color="green">My answer — Challenge 1 (Quaternary System)</font>

**The trend I can find in 60 seconds:** bromide sets the emission colour. Looking across the three Br blocks of the
glyph map, the whole PL band slides blue by about **44 nm for every 1/6 step of Br** — the Bottom PL peak
averages **≈ 789 nm (0% Br) → 746 nm (16.7% Br) → 702 nm (33.3% Br)** — and the absorbance step moves right
along with it. The spectrum that supports it is the **A1 → A5 → A9 ladder** (Evidence 1): same Cs, Rb and DMA,
only Br changes, and both the PL band and the absorbance edge move together.

**What else I found once the overview pointed me there:**

- **DMA and Cs fine-tune the colour.** Inside every Cs/Rb series, adding DMA blue-shifts the band by roughly
  **1.3 nm per % DMA** (≈ 13 nm going from 0 to 10%). In the pure-iodide block, going from Cs 10% to Cs 30% moves
  the band about **12 nm bluer** (≈ 795 → 783 nm). Evidence 2 (A1 vs A4 vs E1) shows those shifts directly.
- **Rb + DMA together make pure-iodide films dim.** The pure-iodide wells with Rb ≥ 5% and any DMA are on average
  about **6–7× dimmer** (log10 band area 4.4 vs 5.2 for the rest of the plate). That corner of the glyph map is
  the pale one, and H2 in Evidence 2 shows it in raw counts (max ≈ 408 vs ≈ 2,350 for A1).
- **Top and Bottom PL basically agree on the colour.** After my robust processing, **91 of 96 wells (95%) have
  Top and Bottom peaks within ±5 nm**, the median difference is only **−1 nm** (Top very slightly bluer), and the
  windowed centroid split is about −1 nm too. The big baseline disagreements collapse: D4 goes from **+58 → −6 nm**
  and H12 from **+155 → −3 nm**. What *does* differ is brightness — Bottom collection gives about **3.2× more**
  signal than Top (median band-area ratio).
- **Absorbance context:** the absorption step sits just on the blue side of the PL peak and follows Br. It is a
  little further from the PL peak for the Cs 30% rows (≈ 10–17 nm) than for the Cs 10% rows (≈ 3–10 nm).
  **H9 is an outlier** I'd flag for a re-check: its absorbance is ~3× higher than every other well (≈ 2.9 vs a median
  ≈ 0.9 at 500 nm) and it is the only well where Top and Bottom are equally bright — that smells like a thicker
  or different film rather than a composition effect.

**One sentence on what became easier to see:** by drawing every spectrum in the plate's own composition grid, I
could see at a glance that Br moves the entire band (and its absorbance edge) in big steps while DMA, Cs and Rb
only nudge it — and that the "Top vs Bottom disagreement" in the baseline map was mostly a weak-signal artifact.

**One possible misinterpretation:** each glyph is scaled to its own maximum, so a very dim well (like H2) looks as
"strong" as a bright one — brightness only lives in the cell shading and the trend plot. A second trap I ran into
myself: a single Top − Bottom number can look like a depth-dependent composition difference when it is really an
edge spike or background, and none of these peak shifts are phase assignments on their own.


<h2><font color="purple">3.</font> Explore the RP-Additive System</h2>

### Problem 2

> **Where do emission bands appear, disappear, or shift with composition and time,
> and do Top and Bottom measurements tell the same story?**

Columns vary the nominal 3AMP/FAPbI3 host mix. Rows vary the nominal MACl design
level. Each well has Top and Bottom PL every 20 minutes from 0 to 380 minutes.

The host fractions form one closed basis. MACl is a separate experimental axis. A
single final-time map hides the trajectory, while 20 separate maps are cumbersome.
The baseline solution pairs a **composition overview at one time** with a
**time × wavelength heatmap** for one selected well.


In [ ]:
# Reusable Challenge 2 composition map at one elapsed time
RP_METRICS = {
    "red_fraction_760_820": "Fraction of PL from 760–820 nm",
    "peak_nm": "Dominant emission (nm)",
    "peak_shift_vs_t0": "Peak shift from t0 (nm)",
    "retention_vs_t0": "Integrated PL / t0",
}
RP_COLORBAR_TITLES = {
    "red_fraction_760_820": "760–820 nm<br>PL fraction",
    "peak_nm": "Peak<br>(nm)",
    "peak_shift_vs_t0": "Peak shift<br>(nm)",
    "retention_vs_t0": "PL / t0",
}

def rp_composition_map(
    measure="Bottom PL", time_min=380, metric="red_fraction_760_820",
    selected_well="H7",
):
    current = rp_features[
        rp_features["measure"].eq(measure)
        & np.isclose(rp_features["time_min"], float(time_min))
    ].copy()
    valid = current[current["qc_status"].eq("valid")]
    all_valid = rp_features[
        rp_features["measure"].eq(measure)
        & rp_features["qc_status"].eq("valid")
    ]
    diverging = metric == "peak_shift_vs_t0"
    if diverging:
        bound = float(np.nanmax(np.abs(all_valid[metric])))
        color_range = [-bound, bound]
    else:
        color_range = [float(all_valid[metric].min()), float(all_valid[metric].max())]

    figure = px.scatter(
        valid, x="FAPbI3_percent", y="additive_percent", color=metric,
        custom_data=["well", "spacer_percent", "qc_status"],
        labels={
            "FAPbI3_percent": "FAPbI3 host (%)",
            "additive_percent": "MACl level (%)",
            metric: RP_METRICS[metric],
        },
        color_continuous_scale="RdBu_r" if diverging else "Viridis",
        range_color=color_range,
        title=(
            f"{measure} at {time_min:g} min"
            f"<br><sup>Color: {RP_METRICS[metric]}</sup>"
        ),
        height=650,
    )
    figure.update_traces(
        marker={"size": 16, "line": {"color": "white", "width": 1}},
        hovertemplate=(
            "<b>Well %{customdata[0]}</b><br>FAPbI3 %{x:.1f}%<br>"
            "3AMP host %{customdata[1]:.1f}%<br>MACl level %{y:g}%<br>"
            "Value %{marker.color:.4g}<extra></extra>"
        ),
    )
    invalid = current[~current["qc_status"].eq("valid")]
    if not invalid.empty:
        figure.add_trace(go.Scatter(
            x=invalid["FAPbI3_percent"], y=invalid["additive_percent"],
            mode="markers", name="Low/invalid PL",
            marker={"size": 13, "symbol": "x", "color": "#6b7280"},
            text=invalid["well"], hovertemplate="Well %{text}<extra></extra>",
        ))
    selected = current[current["well"].eq(selected_well)]
    if not selected.empty:
        figure.add_trace(go.Scatter(
            x=selected["FAPbI3_percent"], y=selected["additive_percent"],
            mode="markers", name=f"Selected: {selected_well}",
            marker={"size": 20, "symbol": "circle-open", "color": "black",
                    "line": {"width": 3}},
            hoverinfo="skip",
        ))
    figure.update_coloraxes(colorbar={
        "title": {"text": RP_COLORBAR_TITLES[metric], "side": "right"},
        "thickness": 18,
        "len": 0.72,
        "x": 1.02,
    })
    figure.update_xaxes(range=[-5, 105], automargin=True)
    figure.update_yaxes(range=[-1, 21.5], automargin=True)
    figure.update_layout(
        template="plotly_white", autosize=True,
        margin={"l": 80, "r": 145, "t": 105, "b": 120},
        title={"x": 0.01, "xanchor": "left"},
        legend={
            "orientation": "h", "yanchor": "top", "y": -0.20,
            "xanchor": "left", "x": 0,
        },
    )
    return figure


In [ ]:
# Reusable Challenge 2 time × wavelength view for one composition
def rp_time_wavelength(well="H7", measure="Bottom PL"):
    rows = rp_features[
        rp_features["well"].eq(well) & rp_features["measure"].eq(measure)
    ].sort_values("time_min")
    matrix = rp_spectra_by_id.loc[
        rows["spectrum_id"], rp_wavelength_columns
    ].to_numpy(float, copy=True)
    valid = rows["qc_status"].eq("valid").to_numpy()
    matrix[~valid] = np.nan
    maxima = np.ones((len(rows), 1))
    maxima[valid] = np.max(matrix[valid], axis=1, keepdims=True)
    matrix = matrix / maxima

    composition = rp_composition[rp_composition["well"].eq(well)].iloc[0]
    subtitle = (
        f"FAPbI3 host {composition.FAPbI3_percent:.1f}% | "
        f"3AMP host {composition.spacer_percent:.1f}% | "
        f"MACl nominal level {composition.additive_percent:g}%"
    )
    figure = go.Figure(go.Heatmap(
        x=rp_wavelengths, y=rows["time_min"], z=matrix,
        zmin=0, zmax=1, colorscale="Magma",
        colorbar={
            "title": {"text": "PL shape<br>(0–1)", "side": "right"},
            "thickness": 18,
            "len": 0.78,
            "x": 1.02,
        },
        hovertemplate="%{x:.0f} nm<br>%{y:.0f} min<br>%{z:.3f}<extra></extra>",
    ))
    figure.update_layout(
        title=f"Well {well} | {measure}<br><sup>{subtitle}</sup>",
        xaxis_title="Wavelength (nm)", yaxis_title="Elapsed time (min)",
        height=650, template="plotly_white", plot_bgcolor="#d1d5db",
        autosize=True, margin={"l": 85, "r": 125, "t": 105, "b": 75},
        title_x=0.01,
    )
    return figure


# Worked Example — RP-Additive System

### Question

Which compositions show strong long-wavelength PL at 380 minutes, and how did the
spectrum of one selected well evolve to that state?

### Baseline solution

The map uses fixed color limits across time. Low/invalid PL is gray rather than being
silently converted to zero. The second figure retains the complete time–wavelength
history for well H7. The figures are stacked at full width for legibility.


In [ ]:
RP_EXAMPLE_WELL = "H7"
RP_EXAMPLE_MEASURE = "Bottom PL"
rp_example_figures = [
    rp_composition_map(
        RP_EXAMPLE_MEASURE, 380, "red_fraction_760_820", RP_EXAMPLE_WELL
    ),
    rp_time_wavelength(RP_EXAMPLE_WELL, RP_EXAMPLE_MEASURE),
]
show_figures(rp_example_figures)

history = rp_features[
    rp_features["well"].eq(RP_EXAMPLE_WELL)
    & rp_features["measure"].eq(RP_EXAMPLE_MEASURE)
].sort_values("time_min")
initial, final = history.iloc[0], history.iloc[-1]
display(Markdown(f'''
### What did we just do?

At **{RP_EXAMPLE_WELL}**, the Bottom-PL dominant maximum
changes from **{initial.peak_nm:.0f} nm** at {initial.time_min:.0f} minutes to
**{final.peak_nm:.0f} nm** at {final.time_min:.0f} minutes. Its 760–820 nm fraction
changes from **{initial.red_fraction_760_820:.3f}** to
**{final.red_fraction_760_820:.3f}**. The heatmap shows whether that scalar change is
a moving band, a competing band, or a change in spectral weight. It is not by itself
evidence of a structural phase transition.
'''))



### What did we just do?

At **H7**, the Bottom-PL dominant maximum
changes from **706 nm** at 0 minutes to
**772 nm** at 380 minutes. Its 760–820 nm fraction
changes from **0.163** to
**0.388**. The heatmap shows whether that scalar change is
a moving band, a competing band, or a change in spectral weight. It is not by itself
evidence of a structural phase transition.


# <font color="red">Challenge 2 — RP-Additive System</font>

### Your task

Improve the baseline so a new user can connect host composition, MACl design level,
time, wavelength, and measurement geometry more quickly or more accurately.

### Possible solutions

- add a time control or animation with a fixed color scale;
- compare Top and Bottom measurements directly;
- encode final − initial change or show a trajectory through time;
- create a wavelength-first composition map;
- link a composition selection to its full spectral history.

### Scientific question

> Where does a spectral feature change, when does it change, and what composition
> context makes that trend understandable?

### Minimum deliverable

One readable visualization, one time-resolved spectral view, one sentence describing
the insight, and one sentence naming a possible misinterpretation.


## <font color="green">How I approached Challenge 2</font>

When I looked at the raw spectra, I saw that **every** read — even the pure-3AMP wells that don't emit at all —
has a tail at 400–450 nm. Because of that tail, the provided `peak_nm` says ~405–420 nm for dark wells, which on a
map looks like blue emission. Also, the provided QC marks *all* Bottom spectra as valid, including those dark ones.
So I started by building features that only look at the real emission region:

- local baseline from 560–600 nm, band search in 560–840 nm, light smoothing;
- a spectrum counts as **"emitting"** only if the band is ≥ 200 instrument units (and QC says valid) — everything
  else is shown as a gray ×, never as zero;
- I split the band into a **short band (660–740 nm)** and a **long band (750–830 nm)** and track
  `long_band_fraction`. These are optical labels, not phase labels.

Then I built the views from overview to evidence:

1. **An animated composition map** with Top and Bottom side by side, one fixed colour scale for all 20 times
   (colour = which band, size = how bright, gray × = no band).
2. **A whole-plate spectral-history mosaic**: one tiny time × wavelength image for every one of the 96 wells,
   laid out as FAPbI3 host fraction (columns) × MACl level (rows). This way nothing is collapsed into one number.
3. **A final − initial change map** on fixed, symmetric scales for both geometries.
4. **A Top-vs-Bottom agreement plot** using every time point where both geometries show a band.
5. **Evidence wells** (H7, F12, C3) with both kymographs and the brightness / band-fraction trajectories.


In [ ]:
# ------------------------------------------------------------
# My Challenge 2, step 1: emission-band features that ignore the blue-end tail
# ------------------------------------------------------------
# When I plotted raw spectra, every read (even the pure-3AMP wells that don't emit)
# has a tail at 400-450 nm. Because of that tail the provided `peak_nm` reports
# ~405-420 nm for dark wells, which looks like "blue emission" on a map. That is
# not a band, so I:
#   * subtract a local baseline (median of 560-600 nm),
#   * search for the emission band only in 560-840 nm (smoothed, 5 points),
#   * call a spectrum "emitting" only if that band is >= 200 instrument units and
#     the provided QC says valid,
#   * split the band area into a SHORT band (660-740 nm) and a LONG band
#     (750-830 nm) and report long_band_fraction = long / (short + long).
# These are descriptive optical labels only, not phase assignments.

EMISSION_THRESHOLD = 200.0
SHORT_BAND = (660, 740)
LONG_BAND = (750, 830)

rp_matrix = rp_spectra_by_id.loc[rp_features["spectrum_id"], rp_wavelength_columns].to_numpy(float)
red_window = (rp_wavelengths >= 560) & (rp_wavelengths <= 840)
local_base = np.median(rp_matrix[:, (rp_wavelengths >= 560) & (rp_wavelengths <= 600)], axis=1, keepdims=True)
rp_clean = np.clip(rp_matrix - local_base, 0, None)
rp_smooth = np.apply_along_axis(lambda y: np.convolve(y, np.ones(5) / 5, mode="same"), 1, rp_clean)
in_red = np.where(red_window, rp_smooth, 0.0)
short_mask = (rp_wavelengths >= SHORT_BAND[0]) & (rp_wavelengths <= SHORT_BAND[1])
long_mask = (rp_wavelengths >= LONG_BAND[0]) & (rp_wavelengths <= LONG_BAND[1])

rp = rp_features.copy()
rp["band_peak_nm"] = rp_wavelengths[np.argmax(in_red, axis=1)]
rp["band_max"] = in_red.max(axis=1)
rp["short_area"] = rp_clean[:, short_mask].sum(axis=1)
rp["long_area"] = rp_clean[:, long_mask].sum(axis=1)
rp["long_band_fraction"] = rp["long_area"] / (rp["short_area"] + rp["long_area"] + 1e-9)
rp["emitting"] = rp["band_max"].ge(EMISSION_THRESHOLD) & rp["qc_status"].eq("valid")
rp["log10_band_max"] = np.log10(rp["band_max"].clip(lower=1))
for column in ["band_peak_nm", "long_band_fraction"]:
    rp.loc[~rp["emitting"], column] = np.nan
rp_clean_by_id = pd.DataFrame(rp_clean, index=rp["spectrum_id"], columns=rp_wavelength_columns)

# One row per well and geometry: first vs last time point
first = rp.sort_values("time_min").groupby(["well", "measure"]).first()
last = rp.sort_values("time_min").groupby(["well", "measure"]).last()
rp_change = pd.DataFrame({
    "FAPbI3_percent": first["FAPbI3_percent"], "additive_percent": first["additive_percent"],
    "band_max_t0": first["band_max"], "band_max_t380": last["band_max"],
    "d_log10_brightness": np.log10((last["band_max"] + 10) / (first["band_max"] + 10)),
    "long_frac_t0": first["long_band_fraction"], "long_frac_t380": last["long_band_fraction"],
    "emitting_t0": first["emitting"], "emitting_t380": last["emitting"],
}).reset_index()
rp_change["d_long_frac"] = rp_change["long_frac_t380"] - rp_change["long_frac_t0"]

dark_note = rp.groupby("measure")["emitting"].agg(lambda s: f"{(~s).sum()} of {len(s)} spectra below threshold")
display(Markdown("**How many spectra I treat as 'no clear emission band':**"))
display(dark_note.to_frame("dark spectra"))


**How many spectra I treat as 'no clear emission band':**

,dark spectra
measure,
Bottom PL,432 of 1920 spectra below threshold
Top PL,708 of 1920 spectra below threshold


In [ ]:
# ------------------------------------------------------------
# My Challenge 2, step 2: the figures
# ------------------------------------------------------------
BAND_COLORSCALE = [[0.0, "#0369a1"], [0.35, "#7dd3fc"], [0.5, "#f5f5f4"],
                   [0.65, "#fca5a5"], [1.0, "#b91c1c"]]
FA_LEVELS = sorted(rp["FAPbI3_percent"].unique())
MACL_LEVELS = sorted(rp["additive_percent"].unique())
TIMES = sorted(rp["time_min"].unique())

def _marker_size(values):
    return np.clip(6 + 4.5 * (np.log10(np.clip(values, 1, None)) - 2.3), 6, 24)


def rp_animated_map():
    """Top and Bottom side by side, a time slider, and one fixed colour scale."""
    measures = ["Bottom PL", "Top PL"]
    figure = make_subplots(rows=1, cols=2, horizontal_spacing=0.08,
                           subplot_titles=[f"{m}" for m in measures])

    def traces_at(t):
        out = []
        for m in measures:
            cur = rp[rp["measure"].eq(m) & np.isclose(rp["time_min"], t)]
            on, off = cur[cur["emitting"]], cur[~cur["emitting"]]
            out.append(go.Scatter(
                x=on["FAPbI3_percent"], y=on["additive_percent"], mode="markers",
                marker={"size": _marker_size(on["band_max"]), "color": on["long_band_fraction"],
                        "coloraxis": "coloraxis", "line": {"color": "white", "width": 1}},
                customdata=np.c_[on["well"], on["band_peak_nm"], on["band_max"]],
                name=f"{m}: emitting", showlegend=False,
                hovertemplate=("<b>Well %{customdata[0]}</b> · " + m +
                               "<br>FAPbI3 host %{x:.0f}% · MACl %{y:g}%"
                               "<br>long-band fraction %{marker.color:.2f}"
                               "<br>band peak %{customdata[1]:.0f} nm"
                               "<br>band height %{customdata[2]:.0f}<extra></extra>")))
            out.append(go.Scatter(
                x=off["FAPbI3_percent"], y=off["additive_percent"], mode="markers",
                marker={"size": 9, "symbol": "x-thin", "line": {"width": 2, "color": "#6b7280"}},
                customdata=off[["well"]], name="no clear band (dark)",
                showlegend=(m == measures[0]),
                hovertemplate="Well %{customdata[0]} · no clear band<extra></extra>"))
        return out

    for i, trace in enumerate(traces_at(TIMES[0])):
        figure.add_trace(trace, row=1, col=1 + i // 2)
    figure.frames = [go.Frame(data=traces_at(t), name=f"{t:g}", traces=list(range(4)))
                     for t in TIMES]
    steps = [{"method": "animate", "label": f"{t:g}",
              "args": [[f"{t:g}"], {"mode": "immediate", "frame": {"duration": 0, "redraw": True},
                                    "transition": {"duration": 0}}]} for t in TIMES]
    figure.update_layout(
        coloraxis={"colorscale": BAND_COLORSCALE, "cmin": 0, "cmax": 1,
                   "colorbar": {"title": {"text": "long-band<br>fraction<br>(750–830 nm)", "side": "right"},
                                "tickvals": [0, 0.5, 1],
                                "ticktext": ["0 = short band<br>(660–740)", "0.5", "1 = long band"],
                                "thickness": 16, "len": 0.8}},
        sliders=[{"steps": steps, "active": 0, "currentvalue": {"prefix": "Elapsed time: ", "suffix": " min"},
                  "pad": {"t": 55}, "x": 0.08, "len": 0.92}],
        updatemenus=[{"type": "buttons", "showactive": False, "x": 0.0, "y": -0.13, "xanchor": "left",
                      "buttons": [{"label": "▶ Play", "method": "animate",
                                   "args": [None, {"frame": {"duration": 450, "redraw": True},
                                                   "fromcurrent": True, "transition": {"duration": 0}}]},
                                  {"label": "❚❚", "method": "animate",
                                   "args": [[None], {"mode": "immediate", "frame": {"duration": 0}}]}]}],
        title=("Which band each composition emits, at every time point (drag the slider or press Play)"
               "<br><sup>Colour = share of PL in the long band; marker size = band height (log); "
               "gray × = no clear band (not zero). Colour limits are fixed for all times and both geometries</sup>"),
        template="plotly_white", height=640, autosize=True, title_x=0.01,
        margin={"l": 80, "r": 40, "t": 110, "b": 150},
        legend={"orientation": "h", "y": 1.02, "x": 1, "xanchor": "right"},
    )
    figure.update_xaxes(title_text="FAPbI3 host fraction (%)  ← more 3AMP | more FAPbI3 →",
                        range=[-6, 106], tickvals=[0, 18, 36, 55, 73, 91, 100])
    figure.update_yaxes(title_text="MACl nominal level (%)", range=[-1.5, 21.5], tickvals=MACL_LEVELS, col=1)
    figure.update_yaxes(range=[-1.5, 21.5], tickvals=MACL_LEVELS, col=2)
    return figure


def rp_plate_kymographs(measure="Bottom PL", wl_range=(600, 840), step_nm=4):
    """All 96 wells: a tiny time x wavelength image per well, laid out like the design."""
    keep = (rp_wavelengths >= wl_range[0]) & (rp_wavelengths <= wl_range[1]) \
        & (np.mod(rp_wavelengths - wl_range[0], step_nm) == 0)
    cols = [c for c, k in zip(rp_wavelength_columns, keep) if k]
    wl = rp_wavelengths[keep]
    smooth_by_id = pd.DataFrame(rp_smooth, index=rp["spectrum_id"], columns=rp_wavelength_columns)
    figure = make_subplots(
        rows=len(MACL_LEVELS), cols=len(FA_LEVELS), shared_xaxes=True, shared_yaxes=True,
        horizontal_spacing=0.004, vertical_spacing=0.01,
        column_titles=[f"{fa:.0f}%" for fa in FA_LEVELS],
        row_titles=[f"{m:g}%" for m in MACL_LEVELS],
    )
    sub = rp[rp["measure"].eq(measure)]
    for (fa, macl), grp in sub.groupby(["FAPbI3_percent", "additive_percent"]):
        grp = grp.sort_values("time_min")
        z = smooth_by_id.loc[grp["spectrum_id"], cols].to_numpy(float, copy=True)
        if grp["emitting"].any():
            z = z / np.nanmax(z[grp["emitting"].to_numpy()])
        z[~grp["emitting"].to_numpy()] = np.nan
        z = np.round(z, 3)
        well = grp["well"].iloc[0]
        figure.add_trace(go.Heatmap(
            x=wl, y=grp["time_min"], z=z, zmin=0, zmax=1, coloraxis="coloraxis",
            name=well,
            hovertemplate=(f"<b>{well}</b> · FAPbI3 {fa:.0f}% · MACl {macl:g}%"
                           "<br>%{x:.0f} nm · %{y:.0f} min<br>scaled PL %{z:.2f}<extra></extra>"),
        ), row=MACL_LEVELS.index(macl) + 1, col=FA_LEVELS.index(fa) + 1)
    figure.update_xaxes(showticklabels=False, ticks="", showgrid=False)
    figure.update_yaxes(showticklabels=False, ticks="", showgrid=False, autorange="reversed")
    for c in range(1, len(FA_LEVELS) + 1):
        figure.update_xaxes(showticklabels=True, tickvals=[700, 800], tickfont={"size": 9},
                            row=len(MACL_LEVELS), col=c)
    for r in range(1, len(MACL_LEVELS) + 1):
        figure.update_yaxes(showticklabels=True, tickvals=[0, 380], tickfont={"size": 9}, row=r, col=1)
    figure.for_each_annotation(lambda a: a.update(font={"size": 11}))
    figure.add_annotation(text="FAPbI3 host fraction →  (each tile: x = wavelength 600–840 nm)",
                          xref="paper", yref="paper", x=0.5, y=-0.06, showarrow=False, font={"size": 13})
    figure.add_annotation(text="MACl nominal level ↓  (each tile: y = time 0 → 380 min, downward)",
                          xref="paper", yref="paper", x=-0.045, y=0.5, textangle=-90,
                          showarrow=False, font={"size": 13})
    figure.update_layout(
        coloraxis={"colorscale": "Magma", "cmin": 0, "cmax": 1,
                   "colorbar": {"title": {"text": "PL scaled to<br>the well's own<br>max over time",
                                          "side": "right"}, "thickness": 14, "len": 0.6}},
        title=(f"Whole-plate spectral history — {measure}"
               "<br><sup>Every well keeps its full time × wavelength map. Gray = no clear band "
               "(dark or invalid), not zero</sup>"),
        template="plotly_white", plot_bgcolor="#cbd5e1", height=900, autosize=True, title_x=0.01,
        margin={"l": 95, "r": 70, "t": 110, "b": 80},
    )
    return figure


def rp_change_map():
    """Final (380 min) minus initial (0 min), Bottom and Top on the same scales."""
    measures = ["Bottom PL", "Top PL"]
    figure = make_subplots(rows=2, cols=2, horizontal_spacing=0.08, vertical_spacing=0.16,
                           subplot_titles=[f"{m}: brightness change (log10 final/initial)" for m in measures]
                           + [f"{m}: change in long-band fraction" for m in measures])
    for c, m in enumerate(measures, start=1):
        cur = rp_change[rp_change["measure"].eq(m)]
        lit = cur[cur["emitting_t0"] | cur["emitting_t380"]]
        dark = cur[~(cur["emitting_t0"] | cur["emitting_t380"])]
        figure.add_trace(go.Scatter(
            x=lit["FAPbI3_percent"], y=lit["additive_percent"], mode="markers",
            marker={"size": 15, "color": lit["d_log10_brightness"], "coloraxis": "coloraxis",
                    "line": {"color": "white", "width": 1}},
            customdata=np.c_[lit["well"], lit["band_max_t0"], lit["band_max_t380"]], showlegend=False,
            hovertemplate=("<b>%{customdata[0]}</b><br>band height %{customdata[1]:.0f} → "
                           "%{customdata[2]:.0f}<br>log10 change %{marker.color:+.2f}<extra></extra>"),
        ), row=1, col=c)
        both = cur[cur["emitting_t0"] & cur["emitting_t380"]]
        figure.add_trace(go.Scatter(
            x=both["FAPbI3_percent"], y=both["additive_percent"], mode="markers",
            marker={"size": 15, "color": both["d_long_frac"], "coloraxis": "coloraxis2",
                    "line": {"color": "white", "width": 1}},
            customdata=np.c_[both["well"], both["long_frac_t0"], both["long_frac_t380"]], showlegend=False,
            hovertemplate=("<b>%{customdata[0]}</b><br>long-band fraction %{customdata[1]:.2f} → "
                           "%{customdata[2]:.2f}<extra></extra>"),
        ), row=2, col=c)
        for r, d in [(1, dark), (2, cur[~(cur["emitting_t0"] & cur["emitting_t380"])])]:
            figure.add_trace(go.Scatter(
                x=d["FAPbI3_percent"], y=d["additive_percent"], mode="markers",
                marker={"size": 9, "symbol": "x-thin", "line": {"width": 2, "color": "#6b7280"}},
                customdata=d[["well"]], name="no clear band at t0 and/or 380 min",
                showlegend=(r == 2 and c == 1),
                hovertemplate="%{customdata[0]}: not comparable (dark)<extra></extra>"), row=r, col=c)
    figure.update_xaxes(title_text="FAPbI3 host fraction (%)", range=[-6, 106])
    figure.update_yaxes(title_text="MACl level (%)", range=[-1.5, 21.5], tickvals=MACL_LEVELS)
    figure.update_layout(
        coloraxis={"colorscale": "RdBu", "cmin": -2, "cmax": 2,
                   "colorbar": {"title": {"text": "log10<br>final/initial", "side": "right"},
                                "y": 0.79, "len": 0.42, "thickness": 14}},
        coloraxis2={"colorscale": BAND_COLORSCALE, "cmin": -0.5, "cmax": 0.5,
                    "colorbar": {"title": {"text": "Δ long-band<br>fraction", "side": "right"},
                                 "y": 0.21, "len": 0.42, "thickness": 14}},
        title=("What changed between 0 and 380 minutes?"
               "<br><sup>Top row: blue = brighter, red = dimmer (±2 decades fixed). Bottom row: red = moved "
               "toward the long band, blue = toward the short band</sup>"),
        template="plotly_white", height=820, autosize=True, title_x=0.01,
        margin={"l": 80, "r": 40, "t": 110, "b": 80},
        legend={"orientation": "h", "y": -0.1, "x": 0},
    )
    return figure


def rp_geometry_agreement():
    """Do Top and Bottom tell the same story? Every time point where both show a band."""
    b = rp[rp["measure"].eq("Bottom PL")].set_index(["well", "time_min"])
    t = rp[rp["measure"].eq("Top PL")].set_index(["well", "time_min"])
    pair = b.join(t, lsuffix="_B", rsuffix="_T")
    pair = pair[pair["emitting_B"] & pair["emitting_T"]].reset_index()
    pair["d_peak"] = pair["band_peak_nm_T"] - pair["band_peak_nm_B"]
    figure = make_subplots(rows=1, cols=2, horizontal_spacing=0.12,
                           subplot_titles=("Long-band fraction: Top vs Bottom",
                                           "Brightness: Bottom ÷ Top band height"))
    figure.add_trace(go.Scatter(
        x=pair["long_band_fraction_B"], y=pair["long_band_fraction_T"], mode="markers",
        marker={"size": 6, "color": pair["FAPbI3_percent_B"], "colorscale": "Viridis", "opacity": 0.65,
                "colorbar": {"title": {"text": "FAPbI3<br>host (%)", "side": "right"}, "thickness": 14,
                             "x": 0.44, "len": 0.8}},
        customdata=np.c_[pair["well"], pair["time_min"], pair["d_peak"]], showlegend=False,
        hovertemplate=("%{customdata[0]} at %{customdata[1]:.0f} min<br>Bottom %{x:.2f} · Top %{y:.2f}"
                       "<br>Top − Bottom peak %{customdata[2]:+.0f} nm<extra></extra>")), row=1, col=1)
    figure.add_trace(go.Scatter(x=[0, 1], y=[0, 1], mode="lines", line={"dash": "dash", "color": "#475569"},
                                showlegend=False, hoverinfo="skip"), row=1, col=1)
    ratio = pair["band_max_B"] / pair["band_max_T"]
    figure.add_trace(go.Box(x=pair["FAPbI3_percent_B"].round(0).astype(int).astype(str), y=ratio,
                            marker={"color": "#ea580c"}, boxpoints=False, showlegend=False,
                            hovertemplate="FAPbI3 %{x}%<br>Bottom/Top %{y:.1f}<extra></extra>"), row=1, col=2)
    figure.update_xaxes(title_text="Bottom PL long-band fraction", range=[-0.02, 1.02], row=1, col=1)
    figure.update_yaxes(title_text="Top PL long-band fraction", range=[-0.02, 1.02], row=1, col=1)
    figure.update_xaxes(title_text="FAPbI3 host fraction (%)", type="category", row=1, col=2)
    figure.update_yaxes(title_text="Bottom ÷ Top band height", type="log", row=1, col=2)
    figure.update_layout(
        title=(f"Top and Bottom agree on WHICH band ({len(pair)} paired spectra), but not on HOW BRIGHT"
               "<br><sup>Points on the dashed line = same band balance in both geometries</sup>"),
        template="plotly_white", height=520, autosize=True, title_x=0.01,
        margin={"l": 80, "r": 40, "t": 110, "b": 80},
    )
    return figure, pair


def rp_well_story(well="H7"):
    """Evidence for one well: both kymographs plus the two trajectories."""
    comp = rp_composition[rp_composition["well"].eq(well)].iloc[0]
    figure = make_subplots(rows=2, cols=2, vertical_spacing=0.16, horizontal_spacing=0.1,
                           subplot_titles=("Bottom PL (time × wavelength)", "Top PL (time × wavelength)",
                                           "Band height vs time", "Long-band fraction vs time"))
    colors = {"Bottom PL": "#ea580c", "Top PL": "#2563eb"}
    for c, m in enumerate(["Bottom PL", "Top PL"], start=1):
        rows = rp[rp["well"].eq(well) & rp["measure"].eq(m)].sort_values("time_min")
        z = rp_clean_by_id.loc[rows["spectrum_id"]].to_numpy(float, copy=True)
        sel = (rp_wavelengths >= 560) & (rp_wavelengths <= 840)
        z = z[:, sel]
        good = rows["emitting"].to_numpy()
        if good.any():
            z = z / np.nanmax(z[good])
        z[~good] = np.nan
        z = np.round(z, 3)
        figure.add_trace(go.Heatmap(x=rp_wavelengths[sel], y=rows["time_min"], z=z, zmin=0, zmax=1,
                                    coloraxis="coloraxis",
                                    hovertemplate="%{x:.0f} nm · %{y:.0f} min<br>scaled %{z:.2f}<extra></extra>"),
                         row=1, col=c)
        figure.add_trace(go.Scatter(x=rows["time_min"], y=rows["band_max"].clip(lower=1), mode="lines+markers",
                                    name=m, line={"color": colors[m]},
                                    marker={"symbol": np.where(good, "circle", "x"), "size": 7},
                                    hovertemplate=m + " %{x:.0f} min: %{y:.0f}<extra></extra>"),
                         row=2, col=1)
        figure.add_trace(go.Scatter(x=rows["time_min"], y=rows["long_band_fraction"], mode="lines+markers",
                                    name=m, showlegend=False, line={"color": colors[m]},
                                    customdata=rows[["band_peak_nm"]],
                                    hovertemplate=(m + " %{x:.0f} min: %{y:.2f}"
                                                   "<br>band peak %{customdata[0]:.0f} nm<extra></extra>")),
                         row=2, col=2)
    figure.add_trace(go.Scatter(x=[TIMES[0], TIMES[-1]], y=[EMISSION_THRESHOLD] * 2, mode="lines",
                                name=f"emission threshold ({EMISSION_THRESHOLD:.0f})",
                                line={"dash": "dot", "color": "#6b7280"}, hoverinfo="skip"),
                     row=2, col=1)
    for c in (1, 2):
        figure.update_xaxes(title_text="Wavelength (nm)", row=1, col=c)
        figure.update_yaxes(title_text="Elapsed time (min)", autorange="reversed", row=1, col=c)
        figure.update_xaxes(title_text="Elapsed time (min)", row=2, col=c)
    figure.update_yaxes(title_text="band height (instr. units)", type="log", row=2, col=1)
    figure.update_yaxes(title_text="long-band fraction", range=[-0.02, 1.02], row=2, col=2)
    figure.update_layout(
        coloraxis={"colorscale": "Magma", "cmin": 0, "cmax": 1,
                   "colorbar": {"title": {"text": "PL scaled to<br>own max", "side": "right"},
                                "y": 0.79, "len": 0.42, "thickness": 14}},
        title=(f"Well {well} — FAPbI3 host {comp.FAPbI3_percent:.0f}% · 3AMP host {comp.spacer_percent:.0f}% · "
               f"MACl {comp.additive_percent:g}%<br><sup>Gray rows / × markers = no clear band at that time</sup>"),
        template="plotly_white", plot_bgcolor="#e5e7eb", height=820, autosize=True, title_x=0.01,
        margin={"l": 80, "r": 40, "t": 110, "b": 80},
        legend={"orientation": "h", "y": -0.1, "x": 0},
    )
    return figure


In [ ]:
# ============================================================
# YOUR CODE STARTS HERE — Challenge 2
# ============================================================

CHALLENGE2_MEASURE = "Bottom PL"
CHALLENGE2_TIME_MIN = 380
CHALLENGE2_METRIC = "red_fraction_760_820"   # baseline metric, kept for reference
CHALLENGE2_WELL = "H7"

agreement_figure, rp_pairs = rp_geometry_agreement()

# My final Challenge 2 answer: overview with time control -> whole-plate history ->
# what changed -> do the geometries agree -> the evidence wells.
challenge2_figures = [
    rp_animated_map(),
    rp_plate_kymographs("Bottom PL"),
    rp_plate_kymographs("Top PL"),
    rp_change_map(),
    agreement_figure,
    rp_well_story(CHALLENGE2_WELL),   # band switch late in the run
    rp_well_story("F12"),             # pure FAPbI3 host: bright at t0, dark by 20 min
    rp_well_story("C3"),              # short band that brightens ~50x without moving
]

# Numbers I quote in my written answer
bottom = rp_change[rp_change["measure"].eq("Bottom PL")]
col12 = bottom[np.isclose(bottom["FAPbI3_percent"], 100)]
short_cols = bottom[bottom["FAPbI3_percent"].round(0).isin([18, 36])]
long_cols = bottom[bottom["FAPbI3_percent"].round(0).isin([64, 73, 82, 91])]
t0_bottom = rp[rp["measure"].eq("Bottom PL") & rp["time_min"].eq(0) & rp["emitting"]]
long_pairs = rp_pairs[rp_pairs["long_band_fraction_B"] > 0.5]
h7 = rp[rp["well"].eq("H7") & rp["measure"].eq("Bottom PL")].sort_values("time_min")
f12 = rp[rp["well"].eq("F12") & rp["measure"].eq("Bottom PL")].sort_values("time_min")
challenge2_numbers = {
    "short_band_peak_nm (FA 9–36%, t0)": t0_bottom[t0_bottom["FAPbI3_percent"].between(5, 40)]["band_peak_nm"].median(),
    "long_band_peak_nm (FA 55–91%, t0)": t0_bottom[t0_bottom["FAPbI3_percent"].between(50, 95)]["band_peak_nm"].median(),
    "col 12 median log10 change": col12["d_log10_brightness"].median(),
    "col 12 wells emitting at 380 min": int(col12["emitting_t380"].sum()),
    "FA 18% & 36% median log10 change": short_cols["d_log10_brightness"].median(),
    "FA 64–91% median log10 change": long_cols["d_log10_brightness"].median(),
    "pure 3AMP wells emitting (any time, Bottom)": int(rp[rp["measure"].eq("Bottom PL") & np.isclose(rp["FAPbI3_percent"], 0)]["emitting"].sum()),
    "paired spectra (both geometries emitting)": len(rp_pairs),
    "median |Δ long-band fraction| Top vs Bottom": (rp_pairs["long_band_fraction_T"] - rp_pairs["long_band_fraction_B"]).abs().median(),
    "median Top − Bottom peak, long-band spectra (nm)": long_pairs["d_peak"].median(),
    "median Bottom/Top brightness": (rp_pairs["band_max_B"] / rp_pairs["band_max_T"]).median(),
    "H7 long-band fraction t0": h7["long_band_fraction"].iloc[0],
    "H7 long-band fraction 380": h7["long_band_fraction"].iloc[-1],
    "H7 band peak t0": h7["band_peak_nm"].iloc[0],
    "H7 band peak 380": h7["band_peak_nm"].iloc[-1],
    "F12 band height t0": f12["band_max"].iloc[0],
    "F12 band height 20 min": f12["band_max"].iloc[1],
}
display(pd.Series(challenge2_numbers).round(3).to_frame("value"))

# Long-band fraction at t0 for the 45% and 55% FAPbI3 columns across MACl (Bottom PL)
boundary = rp[rp["measure"].eq("Bottom PL") & rp["time_min"].isin([0, 380])
              & rp["FAPbI3_percent"].round(0).isin([45, 55])]
display(Markdown("**Long-band fraction at the host-composition boundary (Bottom PL):**"))
display(boundary.pivot_table(index="additive_percent", columns=[boundary["FAPbI3_percent"].round(0), "time_min"],
                             values="long_band_fraction").round(2))

# ============================================================
# YOUR CODE ENDS HERE
# ============================================================
show_figures(challenge2_figures)


,value
"short_band_peak_nm (FA 9–36%, t0)",709.000
"long_band_peak_nm (FA 55–91%, t0)",788.000
col 12 median log10 change,-0.947
col 12 wells emitting at 380 min,1.000
FA 18% & 36% median log10 change,1.177
FA 64–91% median log10 change,-0.131
"pure 3AMP wells emitting (any time, Bottom)",0.000
paired spectra (both geometries emitting),1211.000
median |Δ long-band fraction| Top vs Bottom,0.024
"median Top − Bottom peak, long-band spectra (nm)",-4.000


**Long-band fraction at the host-composition boundary (Bottom PL):**

FAPbI3_percent    45.0        55.0      
time_min         0.0   380.0 0.0   380.0
additive_percent                        
0.0               0.83  0.79  0.94  0.94
1.0               0.76  0.73  0.94  0.96
2.5               0.77  0.74  0.94  0.95
5.0               0.50  0.50  0.94  0.96
7.5               0.70  0.64  0.92  0.95
10.0              0.11  0.19  0.66  0.83
15.0              0.50  0.55  0.68  0.87
20.0              0.03  0.06  0.29  0.55

## <font color="green">My answer — Challenge 2 (RP-Additive System)</font>

**Where do bands appear, disappear or shift?** The host mix decides *which* band you get, MACl decides it only near
the boundary, and time mostly changes *how bright* it is.

- **Host fraction picks the band.** Wells with 9–36% FAPbI3 emit in a short band around **≈ 709 nm**; wells with
  55–91% FAPbI3 emit in a long band around **≈ 788 nm**. Pure 3AMP (0% FAPbI3) never shows a band at any time
  (0 of its Bottom spectra pass my threshold). The 27% column is oddly weak and flickers on/off between neighbours
  that are clearly bright — I'd treat that column as a suspected preparation/dispense issue rather than chemistry.
- **MACl matters at the boundary (45–55% FAPbI3).** At 45% FAPbI3 the long-band fraction at t = 0 is **0.83 with
  no MACl** but **0.11 at 10%** and **0.03 at 20% MACl**; at 55% FAPbI3 it drops from 0.94 (≤ 7.5% MACl) to
  **0.29 at 20% MACl**. So more MACl pushes those mixed hosts toward the short band (not perfectly monotonic —
  the 5% and 15% rows sit in between).
- **When does it change?** The clearest late change is **H7** (55% FAPbI3, 20% MACl): in Bottom PL the band balance
  stays flat for the first ~2 hours, then the long band grows from about 160 min onward — long-band fraction
  **0.29 → 0.55** and the band maximum **708 → 768 nm** by 380 min. The heatmap shows this is a second band growing
  in, not one band sliding.
- **Brightness over time:** the short-band wells (18% and 36% FAPbI3) get brighter by a median **~15×** over 380
  minutes without moving (C3 goes from ≈ 320 to ≈ 16,600 counts and stays at ~700 nm). The long-band wells (64–91%)
  dim only slightly (median ≈ −26%). The **100% FAPbI3 column collapses**: median ~9× dimmer, only 1 of 8 wells
  still has a band at 380 min, and F12 drops from ≈ 21,900 to ≈ 19 counts within the **first 20 minutes**.

**Do Top and Bottom tell the same story?** Mostly yes for *which* band: across 1,211 paired spectra the median
difference in long-band fraction is only **0.02**, and only ~8% differ by more than 0.15. For long-band spectra the
Top peak is about **4 nm bluer**, and Bottom is about **4.5× brighter** overall. The real disagreement is
concentrated in the boundary wells (H7, D6, B6, A5/A6, G5/G6): in H7 the Top signal shows the long band much
earlier and stronger (0.42 → 0.86) than Bottom (0.29 → 0.55). Top also goes dark more often (708 vs 432 spectra
below threshold), so a missing Top band is not the same as a missing Bottom band.

**One sentence on what became easier to see:** with the full spectral history of all 96 wells on one plate-shaped
mosaic and a time slider with fixed colours, I could see in one pass that the host fraction sets the band, MACl
only matters at the 45–55% boundary, short-band films brighten over time, and pure FAPbI3 dies within minutes.

**One possible misinterpretation:** the mosaic scales each well to its own maximum, so a dim well can look as
bright as a strong one, and the short/long "band" labels (or the provided ~410 nm `peak_nm` of dark wells) could
easily be read as phase assignments or real blue emission — they are only descriptive optical windows.


<h2><font color="purple">4.</font> Build, Test, and Explain Your Design</h2>

Use a **60-second usability test**: hand the visualization to someone from another team
and ask them to answer your scientific question without coaching.

Score one point for each:

1. **Dimensional fidelity:** important variables are shown, encoded, or selectable.
2. **Overview + evidence:** a trend can be found and its spectra inspected.
3. **Spectral honesty:** summaries do not masquerade as phase assignments.
4. **Comparable scales + QC:** time/geometry comparisons use defensible scales, and
   low/invalid PL is visibly distinct from measured zero.
5. **One-minute usability:** a new user can answer the stated question.


### <font color="green">My self-check against the 5-point rubric</font>

I didn't have a person from another team on hand, so I did the 60-second test on myself with fresh eyes: I opened the
exported HTML, hid my notes, and tried to answer the scientific question from the figures alone.

| Criterion | Challenge 1 | Challenge 2 |
|---|---|---|
| **Dimensional fidelity** | Cs, Rb, DMA, Br are the grid axes; FA/I fractions are in the hover; Top, Bottom and absorbance are all drawn in every cell. ✔ | FAPbI3 host fraction and MACl are the axes, time is a slider / kymograph axis, Top and Bottom are side by side. ✔ |
| **Overview + evidence** | Glyph map → trend plot → A1/A5/A9 and A1/A4/E1/H2 spectra → dropdown for any well. ✔ | Animated map + mosaic → change map → H7 / F12 / C3 full histories. ✔ |
| **Spectral honesty** | Robust peaks only as navigation; the full spectra are always one glance away; no phase labels. ✔ | "Short / long band" are wavelength windows, the mosaic shows the actual spectra; no phase labels. ✔ |
| **Comparable scales + QC** | Same 650–850 nm window in every cell; weak Top reads flagged in red in the sanity check. ✔ | One fixed colour scale over all times and both geometries; dark/invalid spectra are gray ×, never zero. ✔ |
| **One-minute usability** | "Which variable moves the colour most?" → Br, in well under a minute. ✔ | "Which compositions change, and when?" → boundary wells late in the run, pure FAPbI3 early. ✔ |


In [ ]:
# @title 5. Team result — edit these three fields
TEAM_NAME = "Surya" # @param {type:"string"}
CHOSEN_CHALLENGE = "Challenge 2 — RP-Additive System" # @param ["Challenge 1 — Quaternary System", "Challenge 2 — RP-Additive System"]
DESIGN_CLAIM = (
    "I put the full time × wavelength history of all 96 wells on one plate-shaped mosaic and paired it with a "
    "fixed-scale time slider for Top and Bottom, so it became easy to see that the FAPbI3 host fraction picks "
    "the emission band, MACl only matters at the 45–55% boundary (where H7 grows a long band after ~160 min), "
    "short-band films brighten ~15× over time, and pure FAPbI3 goes dark within 20 minutes."
) # @param {type:"string"}

TEAM_FIGURES = (
    challenge1_figures
    if CHOSEN_CHALLENGE.startswith("Challenge 1")
    else challenge2_figures
)
display(Markdown(
    f"### {TEAM_NAME or 'Unnamed team'}\n\n"
    f"**{CHOSEN_CHALLENGE}**\n\n"
    f"{DESIGN_CLAIM or 'Add one sentence explaining what became easier to see.'}\n\n"
    "_I solved both challenges; the Challenge 1 figures are shown above and both are exported below._"
))
show_figures(TEAM_FIGURES)


### Surya

**Challenge 2 — RP-Additive System**

I put the full time × wavelength history of all 96 wells on one plate-shaped mosaic and paired it with a fixed-scale time slider for Top and Bottom, so it became easy to see that the FAPbI3 host fraction picks the emission band, MACl only matters at the 45–55% boundary (where H7 grows a long band after ~160 min), short-band films brighten ~15× over time, and pure FAPbI3 goes dark within 20 minutes.

_I solved both challenges; the Challenge 1 figures are shown above and both are exported below._

In [ ]:
# @title 6. Export the final interactive result
# I export both of my solutions as standalone interactive HTML files (plotly.js embedded,
# so they open offline in any browser). In Colab they appear in the Files panel (folder
# icon on the left); tick DOWNLOAD_HTML to download them straight to your computer.
DOWNLOAD_HTML = False # @param {type:"boolean"}

safe_team = "".join(
    character if character.isalnum() or character in "-_" else "_"
    for character in (TEAM_NAME.strip() or "unnamed_team")
)
export_dir = Path("/content" if IN_COLAB else ".")
exports = {
    "Challenge 1 — Quaternary System": (challenge1_figures, f"{safe_team}_Challenge1_Quaternary_solution.html"),
    "Challenge 2 — RP-Additive System": (challenge2_figures, f"{safe_team}_Challenge2_RP_Additive_solution.html"),
}
for challenge, (figures, filename) in exports.items():
    export_path = export_figure_grid(figures, export_dir / filename, f"{TEAM_NAME} — {challenge}")
    print("Wrote", export_path)
    if IN_COLAB and DOWNLOAD_HTML:
        from google.colab import files
        files.download(str(export_path))
    elif not IN_COLAB:
        display(FileLink(str(export_path), result_html_prefix="Download interactive HTML: "))

Wrote /content/Surya_Challenge1_Quaternary_solution.html
Wrote /content/Surya_Challenge2_RP_Additive_solution.html


## Final Discussion

Be ready to answer:

1. What became easier to see?
2. Which dimensions are directly shown, encoded, selected, or omitted?
3. What could the design cause someone to assume incorrectly?
4. Does the conclusion still hold when the full spectra are inspected?
5. What would you change with another hour?

---

## <font color="green">Takeaway</font>

A useful higher-dimensional visualization does not merely make the plot look compact.
It preserves the scientific variables, exposes comparison choices, distinguishes bad
signal from measured zero, and keeps the underlying spectra inspectable.


## <font color="green">My answers to the Final Discussion</font>

**1. What became easier to see?**
For Challenge 1, I can see straight away that Br moves the whole emission band (and its absorbance edge) in big
~44 nm steps while DMA, Cs and Rb only nudge it, and that Top and Bottom actually agree on the colour. For
Challenge 2, I can see the whole plate's history at once: the host fraction picks the band, MACl only matters at
the 45–55% FAPbI3 boundary, short-band films brighten over time, and pure FAPbI3 goes dark within the first 20
minutes.

**2. Which dimensions are shown, encoded, selected, or omitted?**
- *Challenge 1:* Cs, Rb, Br and DMA are **shown** as grid position; wavelength is **shown** inside each cell; Top,
  Bottom and absorbance are **shown** as three lines; brightness is **encoded** as cell shading; FA and I fractions
  are in the **hover** (they're fixed by the others); any single well can be **selected** in the dropdown. I
  **omitted** the Cl fraction because it is zero everywhere.
- *Challenge 2:* FAPbI3 host fraction and MACl are **shown** as position; time is **selected** with the slider and
  **shown** as the vertical axis of each mosaic tile; wavelength is **shown** in the tiles and **encoded** as the
  long-band fraction in the map; Top vs Bottom are **shown** side by side; brightness is **encoded** as marker
  size. The 3AMP fraction isn't drawn separately because it is simply 100% − FAPbI3.

**3. What could the design cause someone to assume incorrectly?**
Both overviews scale each well to its own maximum, so a dim well can look as convincing as a bright one. Someone
could also read the "short/long band" labels or a peak shift as a phase identification, or read a gray × as
"zero light" when it really means "no clear band above threshold / failed QC". And in Challenge 2 the MACl axis is
drawn on a linear scale, but those percentages are nominal design labels with an undocumented basis, so it
shouldn't be read as a true concentration scale.

**4. Does the conclusion still hold when the full spectra are inspected?**
Yes — that's why I put the spectra first. The Br ladder (A1/A5/A9) shows the full band and the absorbance step
moving together. When I inspected D4 and H12, the huge baseline Top−Bottom differences turned out to be 850 nm
edge spikes, and the bands themselves agree within a few nm. In Challenge 2, the H7 kymograph confirms a second
band growing in (not one band sliding), C3 confirms brightening without a shift, and F12 confirms a real collapse
rather than a QC glitch, because both geometries drop together at 20 minutes.

**5. What would I change with another hour?**
I'd (a) link the overview to the evidence with click-selection (ipywidgets `FigureWidget` or a small Dash app) so
clicking a glyph or marker opens its spectra; (b) fit each spectrum with two Gaussians instead of using fixed
wavelength windows, which would give cleaner band positions and amplitudes; (c) add an uncertainty estimate by
comparing neighbouring time points as pseudo-replicates; and (d) re-check the 27% FAPbI3 column and well H9 against
the plate-reader workbook, since both look like preparation outliers.


## Optional Appendix — Data Provenance and Limits

**Quaternary System:** 96 static wells; one Top PL, Bottom PL, and absorbance read per well.
Nominal composition fractions assume equal-molar stocks. Stock concentrations and
solvents are not included.

**RP-Additive System:** 96 wells × 20 times × two geometries = 3,840 PL spectra. The MACl
percentage is a nominal design label with undocumented denominator. The dispense table
was reconstructed from project plate-layout code and cross-checked against all 96
metadata labels; it was not parsed from the plate-reader workbook.

Each downloaded challenge folder includes `README_DATA.md` and `SHA256SUMS.txt` for a
fuller field description and file-integrity record.


**Bundled copy:** the files unpacked in step 2b are byte-for-byte the files from the challenge's Google Drive folder (including both `README_DATA.md` files); their SHA-256 hashes are listed in step 2a.